# **Project Name**    - **🧠 Brain Tumor MRI Image Classification**
### Custom CNN vs Transfer Learning (MobileNetV2 · EfficientNetB0 · ResNet50V2) with Grad-CAM explainability and a Streamlit app



<img src="https://miro.medium.com/1*l83-JpmYdbv1Cx0RWI1w3w.jpeg" jsaction="" class="sFlh5c FyHeAf uT7N3d" style="max-width: 580px; --xGflle: 1.4720812182741116;" alt="Brain Tumor Classification using Deep Learning | by Manu Siddhartha | Medium" jsname="kn3ccd">

##### **Project Type**    - Classification (Deep Learning · Medical Imaging · Computer Vision)
##### **Contribution**    - Individual
##### **Domain -**          Innovexis Data Science & Gen AI
##### **Team Member  -**    P Suman Sangeet (PGDM in Big Data Analytics)


# **Project Summary -**

Write the summary here within 500-600 words.

**Brain Tumor MRI Image Classification** is an end-to-end deep-learning project that classifies brain MRI slices into four classes - *glioma*, *meningioma*, *pituitary tumor* and *no tumor* - and serves the best model through a Streamlit web app for real-time predictions.

**Data.** 2,443 labelled MRI images (640x640 JPEG, stored as RGB but effectively grayscale) from a Roboflow-hosted dataset: glioma 805, pituitary 610, meningioma 545, no tumor 483 (imbalance ratio 1.67:1, handled with class weights).

**What the EDA revealed before any modelling.**
1. *Acquisition signatures.* The classes differ systematically in brightness, brain-foreground coverage, sharpness and JPEG file size (glioma images are the darkest with ~41 % foreground; pituitary the largest with ~66 %). Kruskal-Wallis and ANOVA confirm these differences are statistically overwhelming (p < 1e-100). A Random Forest trained on only six crude intensity statistics reaches ~83 % accuracy under group-aware cross-validation - a warning that a CNN could "cheat" on framing/intensity instead of pathology. I therefore verify every model with Grad-CAM.
2. *Data leakage.* 352 source scans occur twice (augmented copies) and 164 source IDs straddle the vendor's train/valid/test folders - 67 of the 246 test images have a sibling in train/valid, which inflates test scores. I pooled all images and re-split with `StratifiedGroupKFold` on the source ID (~67/17/17), asserting zero overlap in code.

**Modelling.** Images are resized to 224x224, scaled per backbone, and augmented *inside* the model (flips, rotation, zoom, translation, brightness, contrast). Four models are compared: a custom CNN from scratch (4 conv stages, BatchNorm, Dropout, Global Average Pooling) and three ImageNet backbones - MobileNetV2, EfficientNetB0, ResNet50V2 - used first as frozen feature extractors. Tuning combines random search with stratified-group K-fold cross-validation (the custom CNN end-to-end; the transfer heads on cached embeddings) followed by two-phase fine-tuning of the top backbone layers at a low learning rate. EarlyStopping, ModelCheckpoint and ReduceLROnPlateau control training.

**Evaluation.** Accuracy, macro precision / recall / F1, one-vs-rest ROC-AUC, confusion matrices, per-class reports, parameter count, model size and inference latency feed an interactive leaderboard. The final model is chosen on *validation* macro-F1 (never on test) with efficiency as a tie-breaker, then explained with Grad-CAM.

**Deployment.** The best model is saved as `.h5` together with a metadata file, and `app.py` lets a user upload an MRI, see the predicted class, confidence, class-probability chart and a Grad-CAM overlay, plus a clear "not a medical device" disclaimer.

**Business value and caution.** Such a tool can speed up radiology triage, support second opinions in under-resourced settings and help segment research cohorts. It is a decision-support prototype: external validation on multi-centre data, calibration and radiologist-in-the-loop review are required before any clinical use. Final metrics are generated live by the notebook (Section 7 leaderboard and the Conclusion scoreboard).

# **GitHub Link -**

Provide your GitHub Link here.

# **Problem Statement**


**Write Problem Statement Here.**

 Radiologists must distinguish glioma, meningioma and pituitary tumors from tumor-free scans on large MRI worklists, which is slow and subject to inter-reader variability. The goal is to build a deep-learning system that

1. classifies a brain MRI into **glioma / meningioma / pituitary / no tumor**,
2. compares a **custom CNN built from scratch** against **transfer-learning** backbones (ImageNet weights, optional fine-tuning),
3. is evaluated honestly (leakage-free split, macro-averaged metrics, confusion matrices, Grad-CAM), and
4. is deployed as a **Streamlit** app that returns the predicted tumor type with a confidence score.

# **General Guidelines** : -  

1.   Well-structured, formatted, and commented code is required.
2.   Exception Handling, Production Grade Code & Deployment Ready Code will be a plus. Those students will be awarded some additional credits.
     
     The additional credits will have advantages over other students during Star Student selection.
       
             [ Note: - Deployment Ready Code is defined as, the whole .ipynb notebook should be executable in one go
                       without a single error logged. ]

3.   Each and every logic should have proper comments.
4. You may add as many number of charts you want. Make Sure for each and every chart the following format should be answered.
        

```
# Chart visualization code
```
            

*   Why did you pick the specific chart?
*   What is/are the insight(s) found from the chart?
* Will the gained insights help creating a positive business impact?
Are there any insights that lead to negative growth? Justify with specific reason.

5. You have to create at least 15 logical & meaningful charts having important insights.


[ Hints : - Do the Vizualization in  a structured way while following "UBM" Rule.

U - Univariate Analysis,

B - Bivariate Analysis (Numerical - Categorical, Numerical - Numerical, Categorical - Categorical)

M - Multivariate Analysis
 ]





6. You may add more ml algorithms for model creation. Make sure for each and every algorithm, the following format should be answered.


*   Explain the ML Model used and it's performance using Evaluation metric Score Chart.


*   Cross- Validation & Hyperparameter Tuning

*   Have you seen any improvement? Note down the improvement with updates Evaluation metric Score Chart.

*   Explain each evaluation metric's indication towards business and the business impact pf the ML model used.




















# ***Let's Begin !***

## ***1. Know Your Data***

### Import Libraries

In [3]:
import sys
import tensorflow as tf
import keras
import plotly
import nbformat

print("Python:", sys.version)
print("TensorFlow:", tf.__version__)
print("Keras:", keras.__version__)
print("Plotly:", plotly.__version__)
print("nbformat:", nbformat.__version__)
print("GPU:", tf.config.list_physical_devices("GPU"))

Python: 3.11.15 | packaged by Anaconda, Inc. | (main, Jun 11 2026, 15:12:53) [MSC v.1942 64 bit (AMD64)]
TensorFlow: 2.21.0
Keras: 3.15.0
Plotly: 7.1.0
nbformat: 5.11.1
GPU: []


In [4]:
# Import Libraries

# ── Import Libraries ─────────────────────────────────────────────────────────
import importlib.util, subprocess, sys

# Auto-install anything that is missing (TensorFlow only if it is absent).
_REQ = {"numpy": "numpy", "pandas": "pandas", "PIL": "pillow", "scipy": "scipy",
        "sklearn": "scikit-learn", "plotly": "plotly", "matplotlib": "matplotlib",
        "nbformat": "nbformat", "joblib": "joblib", "tensorflow": "tensorflow"}
_missing = [pip for mod, pip in _REQ.items() if importlib.util.find_spec(mod) is None]
if _missing:
    print("Installing missing packages:", _missing)
    subprocess.check_call([sys.executable, "-m", "pip", "install", "-q", *_missing])

import os, io, re, gc, json, time, zipfile, random, hashlib, platform, warnings
from pathlib import Path
import numpy as np
import pandas as pd
from PIL import Image
from scipy import stats, ndimage as ndi
import matplotlib.pyplot as plt

import plotly.express as px
import plotly.graph_objects as go
import plotly.io as pio
from plotly.subplots import make_subplots

from sklearn.model_selection import StratifiedGroupKFold, cross_val_predict
from sklearn.metrics import (accuracy_score, precision_recall_fscore_support, f1_score,
                             confusion_matrix, classification_report, roc_auc_score, roc_curve)
from sklearn.ensemble import RandomForestClassifier
from sklearn.impute import SimpleImputer
from sklearn.pipeline import make_pipeline
from sklearn.decomposition import PCA
from sklearn.manifold import TSNE
from sklearn.utils.class_weight import compute_class_weight
import joblib
from IPython.display import display, Markdown

os.environ.setdefault("TF_CPP_MIN_LOG_LEVEL", "2")
# Windows/CPU builds can abort training with "could not create a memory object" (oneDNN/MKL MaxPoolGrad);
# disabling the oneDNN fast-path avoids that crash. Must be set BEFORE TensorFlow is imported.
os.environ["TF_ENABLE_ONEDNN_OPTS"] = "0"
import tensorflow as tf
from tensorflow import keras
from tensorflow.keras import layers

warnings.filterwarnings("ignore")
print(f"Python {platform.python_version()} | TensorFlow {tf.__version__} | Keras {keras.__version__}")
print("GPU devices:", tf.config.list_physical_devices("GPU") or "none (running on CPU)")

Python 3.11.15 | TensorFlow 2.21.0 | Keras 3.15.0
GPU devices: none (running on CPU)


### Project configuration (runtime profile, paths, theme)

In [6]:
# Load Dataset
# ── Configuration ────────────────────────────────────────────────────────────
SEED = 42
# "standard": 224 px, full training  |  "quick": 128 px, fewer epochs (CPU-friendly)
# ("smoke" is only used for automated testing)
PROFILE = os.environ.get("MRI_PROFILE", "standard")
PROFILES = {
    "smoke":    dict(img=64,  bs=32, subset=0.12, ep_base=2,  ep_head=2,  ep_ft=1,  ep_search=1, ep_cv=1, head_ep=3,  cv_folds=2, trials=2, tsne_n=300),
    "quick":    dict(img=128, bs=32, subset=1.0,  ep_base=12, ep_head=6,  ep_ft=8,  ep_search=4, ep_cv=5, head_ep=12, cv_folds=3, trials=3, tsne_n=1500),
    "standard": dict(img=224, bs=32, subset=1.0,  ep_base=30, ep_head=10, ep_ft=15, ep_search=6, ep_cv=8, head_ep=20, cv_folds=3, trials=4, tsne_n=2000),
}
CFG = PROFILES[PROFILE]
IMG_SIZE, BATCH_SIZE = CFG["img"], CFG["bs"]
WEIGHTS = None if os.environ.get("MRI_WEIGHTS", "imagenet").lower() == "none" else "imagenet"
LEAKAGE_SAFE_RESPLIT = True      # re-split by source scan to remove train/test leakage

ARTIFACTS = Path("artifacts"); MODELS_DIR = ARTIFACTS / "models"
MODELS_DIR.mkdir(parents=True, exist_ok=True)

random.seed(SEED); np.random.seed(SEED); keras.utils.set_random_seed(SEED)
pio.templates.default = "plotly_white"
pio.renderers.default = "plotly_mimetype+notebook_connected"
print(f"Profile = {PROFILE} | image size = {IMG_SIZE} | ImageNet weights = {WEIGHTS} | leakage-safe re-split = {LEAKAGE_SAFE_RESPLIT}")

Profile = standard | image size = 224 | ImageNet weights = imagenet | leakage-safe re-split = True


### Dataset Loading

In [7]:
# ── Load Dataset ─────────────────────────────────────────────────────────────
# The notebook looks for an extracted dataset folder or for Tumour.zip (set MRI_DATA to override).
def _find_split_root(base: Path):
    """Return the folder that contains train / valid(val) / test sub-folders."""
    for cand in [base, *base.glob("*"), *base.glob("*/*")]:
        if not cand.is_dir():
            continue
        names = {p.name.lower() for p in cand.iterdir() if p.is_dir()}
        if {"train", "test"} <= names and ({"valid", "val", "validation"} & names):
            return cand
    return None

def locate_dataset() -> Path:
    env = os.environ.get("MRI_DATA")
    for b in ([env] if env else []) + ["Tumour", "data", "dataset", "."]:
        if b and Path(b).is_dir() and (root := _find_split_root(Path(b))):
            return root
    zips = ([env] if env and env.endswith(".zip") else []) + [
        "Tumour.zip", "../Tumour.zip", str(Path.home() / "Downloads" / "Tumour.zip"),
        "/content/Tumour.zip", "/mnt/user-data/uploads/Tumour.zip"]
    for z in zips:
        if Path(z).is_file():
            out = Path("data")
            if not out.exists() or not any(out.iterdir()):
                print("Extracting", z, "->", out)
                zipfile.ZipFile(z).extractall(out)
            if root := _find_split_root(out):
                return root
    raise FileNotFoundError("Dataset not found. Put Tumour.zip next to this notebook or set MRI_DATA=/path/to/dataset")

DATA_ROOT = locate_dataset()
print("Dataset root:", DATA_ROOT.resolve())

IMG_EXT = {".jpg", ".jpeg", ".png", ".bmp", ".tif", ".tiff"}
rows = []
for split_dir in sorted(p for p in DATA_ROOT.iterdir() if p.is_dir()):
    split = {"val": "valid", "validation": "valid"}.get(split_dir.name.lower(), split_dir.name.lower())
    for cls_dir in sorted(p for p in split_dir.iterdir() if p.is_dir()):
        for f in sorted(cls_dir.iterdir()):
            if f.suffix.lower() in IMG_EXT:
                with Image.open(f) as im:                       # lazy: reads the header only
                    w, h, mode = im.size[0], im.size[1], im.mode
                rows.append(dict(path=str(f), filename=f.name, original_split=split, label=cls_dir.name,
                                 width=w, height=h, mode=mode, file_kb=f.stat().st_size / 1024))
df = pd.DataFrame(rows)

# Roboflow names look like  Tr-gl_0125_jpg.rf.<hash>.jpg  -> the part before "_jpg.rf." is the source scan ID
df["source_id"] = (df.filename.str.extract(r"^(.*?)_(?:jpg|jpeg|png)\.rf\.", expand=False)
                   .fillna(df.filename.str.rsplit(".", n=1).str[0]))

if CFG["subset"] < 1:                                           # only used by the automated smoke test
    df = df.groupby("label", group_keys=False).sample(frac=CFG["subset"], random_state=SEED).reset_index(drop=True)

CLASS_NAMES = sorted(df.label.unique())
CLASS_COLORS = dict(zip(CLASS_NAMES, ["#E4572E", "#17BEBB", "#76B041", "#4361EE"]))
N_CLASSES = len(CLASS_NAMES)

# ---- small helpers reused throughout the notebook ----
def load_rgb(path, size=None):
    """Fast JPEG load (uses DCT down-scaling) -> uint8 RGB array."""
    with Image.open(path) as im:
        if size:
            im.draft("RGB", (size * 2, size * 2))
        im = im.convert("RGB")
        if size:
            im = im.resize((size, size), Image.BILINEAR)
        return np.asarray(im)

def montage_fig(frame, n_per_class=5, size=220, title="", seed=SEED):
    """Interactive grid: one row per class, n random MRI slices per row."""
    classes = sorted(frame.label.unique())
    fig = make_subplots(rows=len(classes), cols=n_per_class, horizontal_spacing=0.004,
                        vertical_spacing=0.02, row_titles=classes)
    for r, c in enumerate(classes, 1):
        sub = frame[frame.label == c]
        sub = sub.sample(min(n_per_class, len(sub)), random_state=seed)
        for k, (_, row) in enumerate(sub.iterrows(), 1):
            fig.add_trace(go.Image(z=load_rgb(row.path, size)), row=r, col=k)
    fig.update_xaxes(visible=False); fig.update_yaxes(visible=False)
    fig.update_layout(title=title, height=170 * len(classes) + 80, margin=dict(l=10, r=70, t=60, b=10))
    return fig

df.sample(3, random_state=SEED)[["filename", "original_split", "label"]]

Dataset root: C:\Users\TECH-GENIUSES\Desktop\INNOVEXIS\Data Science and Gen AI Internship\Project 9 Brain Tumour MRI Classification\Brain Tumor MRI Image Classification\Tumour


,filename,original_split,label
1487,Tr-no_0531_jpg.rf.63d1d307de139298411ff305d788...,train,no_tumor
1808,Tr-pi_0471_jpg.rf.dfb00248bca6aa33dbed1c6c663e...,train,pituitary
1347,Tr-no_0318_jpg.rf.a38f36810b9ff4891d33c2a37bbc...,train,no_tumor


### Dataset First View

In [8]:
# Dataset First Look

# ── Dataset First Look ───────────────────────────────────────────────────────
display(df.head(8))
montage_fig(df, n_per_class=1, size=260, title="One random MRI slice per class").show()

,path,filename,original_split,label,width,height,mode,file_kb,source_id
0,Tumour\test\glioma\Tr-gl_0016_jpg.rf.99746694e...,Tr-gl_0016_jpg.rf.99746694ea97fe0b73108832b462...,test,glioma,640,640,RGB,28.125000,Tr-gl_0016
1,Tumour\test\glioma\Tr-gl_0018_jpg.rf.7a670766b...,Tr-gl_0018_jpg.rf.7a670766b8083a1b516a49e241a6...,test,glioma,640,640,RGB,26.443359,Tr-gl_0018
2,Tumour\test\glioma\Tr-gl_0028_jpg.rf.8098b9737...,Tr-gl_0028_jpg.rf.8098b9737048aac0dccb1b7c4504...,test,glioma,640,640,RGB,31.201172,Tr-gl_0028
3,Tumour\test\glioma\Tr-gl_0032_jpg.rf.e1e485b4f...,Tr-gl_0032_jpg.rf.e1e485b4f909d84c8e24cd26e0ad...,test,glioma,640,640,RGB,31.427734,Tr-gl_0032
4,Tumour\test\glioma\Tr-gl_0035_jpg.rf.7a7c96ab2...,Tr-gl_0035_jpg.rf.7a7c96ab2e6245cf42a0c86b97f8...,test,glioma,640,640,RGB,27.150391,Tr-gl_0035
5,Tumour\test\glioma\Tr-gl_0037_jpg.rf.6ac800868...,Tr-gl_0037_jpg.rf.6ac80086817a5d840d3b63495629...,test,glioma,640,640,RGB,29.141602,Tr-gl_0037
6,Tumour\test\glioma\Tr-gl_0040_jpg.rf.4e8e95e2b...,Tr-gl_0040_jpg.rf.4e8e95e2b510b798b62954aa8d3e...,test,glioma,640,640,RGB,31.833008,Tr-gl_0040
7,Tumour\test\glioma\Tr-gl_0042_jpg.rf.c825249fc...,Tr-gl_0042_jpg.rf.c825249fca17c0579976c6455ed0...,test,glioma,640,640,RGB,21.883789,Tr-gl_0042


### Dataset Rows & Columns count

In [9]:
# Dataset Rows & Columns count
# ── Dataset Rows & Columns count ─────────────────────────────────────────────
print(f"Rows (images): {df.shape[0]:,}  |  Columns (metadata fields): {df.shape[1]}")
display(pd.crosstab(df.original_split, df.label, margins=True, margins_name="Total"))

Rows (images): 2,443  |  Columns (metadata fields): 9


label,glioma,meningioma,no_tumor,pituitary,Total
original_split,,,,,
test,80,63,49,54,246
train,564,358,335,438,1695
valid,161,124,99,118,502
Total,805,545,483,610,2443


### Dataset Information

In [10]:
# Dataset Info
# ── Dataset Info ─────────────────────────────────────────────────────────────
df.info()
print(f"\nTotal image data on disk: {df.file_kb.sum() / 1024:.1f} MB | median file: {df.file_kb.median():.1f} KB")

<class 'pandas.DataFrame'>
RangeIndex: 2443 entries, 0 to 2442
Data columns (total 9 columns):
 #   Column          Non-Null Count  Dtype  
---  ------          --------------  -----  
 0   path            2443 non-null   str    
 1   filename        2443 non-null   str    
 2   original_split  2443 non-null   str    
 3   label           2443 non-null   str    
 4   width           2443 non-null   int64  
 5   height          2443 non-null   int64  
 6   mode            2443 non-null   str    
 7   file_kb         2443 non-null   float64
 8   source_id       2443 non-null   str    
dtypes: float64(1), int64(2), str(6)
memory usage: 171.9 KB

Total image data on disk: 74.4 MB | median file: 30.0 KB


#### Duplicate Values

In [11]:
# Dataset Duplicate Value Count

# ── Dataset Duplicate Value Count ────────────────────────────────────────────
df["md5"] = df.path.map(lambda p: hashlib.md5(Path(p).read_bytes()).hexdigest())
n_exact = int(df.duplicated("md5", keep=False).sum())
multi_src = df.groupby("source_id").size()
audit = pd.DataFrame({
    "check": ["Byte-identical images (MD5)", "Duplicate file names", "Source IDs that occur more than once",
              "Images that share a source ID with another image"],
    "count": [n_exact, int(df.filename.duplicated().sum()), int((multi_src > 1).sum()), int(multi_src[multi_src > 1].sum())]})
display(audit)
print("-> No byte-identical duplicates, but augmented copies share a source ID (checked for leakage in Chart 9).")

,check,count
0,Byte-identical images (MD5),0
1,Duplicate file names,0
2,Source IDs that occur more than once,352
3,Images that share a source ID with another image,704


-> No byte-identical duplicates, but augmented copies share a source ID (checked for leakage in Chart 9).


#### Missing Values/Null Values

In [12]:
# Missing Values/Null Values Count
# ── Missing Values / Null Values Count ───────────────────────────────────────
miss = df.isna().sum().rename("missing").to_frame()
miss["percent"] = (miss.missing / len(df) * 100).round(2)
display(miss[miss.index.isin(["path", "filename", "original_split", "label", "width", "height", "mode", "file_kb", "source_id"])])
print("Total missing cells:", int(df.isna().sum().sum()))

,missing,percent
path,0,0.0
filename,0,0.0
original_split,0,0.0
label,0,0.0
width,0,0.0
height,0,0.0
mode,0,0.0
file_kb,0,0.0
source_id,0,0.0


Total missing cells: 0


In [13]:
# Visualizing the missing values
# ── Visualizing the missing values ───────────────────────────────────────────
cols = ["path", "filename", "original_split", "label", "width", "height", "mode", "file_kb", "source_id"]
fig = px.imshow(df[cols].isna().T.astype(int), aspect="auto", zmin=0, zmax=1,
                color_continuous_scale=["#E8F1FA", "#E4572E"], labels=dict(x="image index", y="column", color="missing"),
                title="Missing-value map (dark red = missing) - the dataset is 100 % complete")
fig.update_layout(height=330, coloraxis_showscale=False)
fig.show()

### What did you know about your dataset?

Answer Here

**Dataset facts (verified in the cells above):**
- **2,443 images**, 4 classes: glioma 805 (32.9 %), pituitary 610 (25.0 %), meningioma 545 (22.3 %), no tumor 483 (19.8 %) - mild imbalance (1.67:1).
- Vendor split: train 1,695 / valid 502 / test 246; class proportions are consistent across splits (chi-square p = 0.47).
- Every image is a **640x640 RGB JPEG** with no missing metadata, no unreadable files and no byte-identical duplicates.
- **Hidden problem:** the file names carry a Roboflow source ID. 352 source scans appear twice (augmented copies) and **164 source IDs are spread across more than one split** -> train/test leakage that I fix by a group-aware re-split (Section 6.8).
- The pixel data is RGB-encoded but **effectively grayscale** (mean R-G difference ~0), so ImageNet backbones can be used directly.

## ***2. Understanding Your Variables***

In [14]:
# Dataset Columns
# ── Dataset Columns ──────────────────────────────────────────────────────────
print(list(df.columns))

['path', 'filename', 'original_split', 'label', 'width', 'height', 'mode', 'file_kb', 'source_id', 'md5']


In [15]:
# Dataset Describe
# ── Dataset Describe ─────────────────────────────────────────────────────────
display(df.describe(include="all").T.drop(columns=["top", "freq"], errors="ignore"))

,count,unique,mean,std,min,25%,50%,75%,max
path,2443,2443,NaN,NaN,NaN,NaN,NaN,NaN,NaN
filename,2443,2443,NaN,NaN,NaN,NaN,NaN,NaN,NaN
original_split,2443,3,NaN,NaN,NaN,NaN,NaN,NaN,NaN
label,2443,4,NaN,NaN,NaN,NaN,NaN,NaN,NaN
width,2443.0,NaN,640.0,0.0,640.0,640.0,640.0,640.0,640.0
height,2443.0,NaN,640.0,0.0,640.0,640.0,640.0,640.0,640.0
mode,2443,1,NaN,NaN,NaN,NaN,NaN,NaN,NaN
file_kb,2443.0,NaN,31.165728,9.092209,16.444336,24.048828,30.009766,36.708008,121.681641
source_id,2443,2091,NaN,NaN,NaN,NaN,NaN,NaN,NaN
md5,2443,2443,NaN,NaN,NaN,NaN,NaN,NaN,NaN


### Variables Description

Answer Here

| Variable | Type | Description |
|---|---|---|
| `path`, `filename` | text | Location / name of the MRI image file |
| `original_split` | categorical | Vendor split (train / valid / test) |
| `label` | categorical (**target**) | glioma, meningioma, pituitary, no_tumor |
| `width`, `height`, `mode` | numeric / text | Image size in pixels and colour mode (all 640x640 RGB) |
| `file_kb` | numeric | JPEG file size in KB (proxy for structural complexity) |
| `source_id` | text | Roboflow source-scan ID; augmented copies share it (used for group-aware splitting) |
| `md5` | text | Content hash for exact-duplicate detection |
| `brightness`, `contrast` | numeric (engineered) | Mean and standard deviation of grayscale intensity (0-255) |
| `fg_ratio` | numeric (engineered) | Share of pixels brighter than 20 (brain/foreground coverage) |
| `sharpness` | numeric (engineered) | Variance of the Laplacian (edge/texture strength) |
| `entropy` | numeric (engineered) | Shannon entropy of the intensity histogram |
| `chroma` | numeric (engineered) | Mean abs(R-G); ~0 means the image is grayscale |
| `label_id` | int (engineered) | Integer-encoded target |
| `split` | categorical (engineered) | Final **leakage-safe** split used for modelling |

### Check Unique Values for each variable.

In [16]:
# Check Unique Values for each variable.

# ── Check Unique Values for each variable ────────────────────────────────────
display(df.nunique().rename("unique_values").to_frame())
for c in ["label", "original_split", "width", "height", "mode"]:
    print(f"\n{c}:"); print(df[c].value_counts().to_string())

,unique_values
path,2443
filename,2443
original_split,3
label,4
width,1
height,1
mode,1
file_kb,2340
source_id,2091
md5,2443



label:
label
glioma        805
pituitary     610
meningioma    545
no_tumor      483

original_split:
original_split
train    1695
valid     502
test      246

width:
width
640    2443

height:
height
640    2443

mode:
mode
RGB    2443


## 3. ***Data Wrangling***

### Data Wrangling Code

In [17]:
# Write your code to make your dataset analysis ready.

# ── Data Wrangling: make the dataset analysis-ready ──────────────────────────
# One pass over every image (128x128 grayscale view) to build interpretable descriptors.
PROF = 128
def image_features(path):
    with Image.open(path) as im:
        im.draft("RGB", (PROF * 2, PROF * 2))
        im = im.convert("RGB").resize((PROF, PROF), Image.BILINEAR)
    rgb = np.asarray(im, dtype=np.float32)
    gray = np.asarray(im.convert("L"), dtype=np.float32)
    hist64, _ = np.histogram(gray, bins=64, range=(0, 255)); p = hist64 / hist64.sum()
    hist32, _ = np.histogram(gray, bins=32, range=(0, 255))
    thumb = np.asarray(Image.fromarray(gray.astype(np.uint8)).resize((32, 32), Image.BILINEAR), dtype=np.float32)
    feats = dict(brightness=gray.mean(), contrast=gray.std(), fg_ratio=(gray > 20).mean(),
                 sharpness=ndi.laplace(gray).var(), entropy=-(p[p > 0] * np.log2(p[p > 0])).sum(),
                 chroma=np.abs(rgb[..., 0] - rgb[..., 1]).mean())
    return feats, hist32 / hist32.sum(), thumb, gray

t0 = time.time()
feat_rows, HIST32, THUMBS = [], [], []
mean_sum = {c: np.zeros((PROF, PROF), np.float64) for c in CLASS_NAMES}
for i, (p, lab) in enumerate(zip(df.path, df.label), 1):
    f, h, t, g = image_features(p)
    feat_rows.append(f); HIST32.append(h); THUMBS.append(t); mean_sum[lab] += g
    if i % 800 == 0:
        print(f"  processed {i:,}/{len(df):,} images ({time.time() - t0:.0f}s)")
HIST32, THUMBS = np.array(HIST32), np.array(THUMBS)
MEAN_IMAGES = {c: mean_sum[c] / (df.label == c).sum() for c in CLASS_NAMES}

df = pd.concat([df.drop(columns=[c for c in ["brightness", "contrast", "fg_ratio", "sharpness", "entropy", "chroma"] if c in df]),
                pd.DataFrame(feat_rows)], axis=1)
df["aspect"] = df.width / df.height
df["label_id"] = df.label.map({c: i for i, c in enumerate(CLASS_NAMES)})
FEATURES = ["brightness", "contrast", "fg_ratio", "sharpness", "entropy", "file_kb"]
print(f"Feature extraction finished in {time.time() - t0:.0f}s")
display(df[["filename", "label", "label_id"] + FEATURES + ["chroma"]].head())
display(df.groupby("label")[FEATURES + ["chroma"]].mean().round(2))

  processed 800/2,443 images (3s)
  processed 1,600/2,443 images (6s)
  processed 2,400/2,443 images (9s)
Feature extraction finished in 10s


,filename,label,label_id,brightness,contrast,fg_ratio,sharpness,entropy,file_kb,chroma
0,Tr-gl_0016_jpg.rf.99746694ea97fe0b73108832b462...,glioma,0,33.598267,39.325306,0.465698,628.029541,3.866590,28.125000,0.0
1,Tr-gl_0018_jpg.rf.7a670766b8083a1b516a49e241a6...,glioma,0,31.049744,33.309067,0.502808,323.249390,3.850161,26.443359,0.0
2,Tr-gl_0028_jpg.rf.8098b9737048aac0dccb1b7c4504...,glioma,0,37.641418,37.262852,0.557312,556.054932,4.168357,31.201172,0.0
3,Tr-gl_0032_jpg.rf.e1e485b4f909d84c8e24cd26e0ad...,glioma,0,48.349854,47.288162,0.536377,660.196167,4.346019,31.427734,0.0
4,Tr-gl_0035_jpg.rf.7a7c96ab2e6245cf42a0c86b97f8...,glioma,0,33.000610,38.630032,0.455322,542.345947,3.546947,27.150391,0.0


,brightness,contrast,fg_ratio,sharpness,entropy,file_kb,chroma
label,,,,,,,
glioma,27.780001,34.889999,0.41,438.500000,3.12,23.53,0.00
meningioma,45.860001,47.150002,0.51,654.890015,4.02,29.33,0.00
no_tumor,59.860001,53.500000,0.61,1436.930054,4.25,39.88,0.01
pituitary,50.250000,39.380001,0.66,770.760010,4.50,35.98,0.00


### What all manipulations have you done and insights you found?

Answer Here.

**Manipulations**
- Built a metadata table from the folder structure (path, vendor split, label) and read image size / mode / file size.
- Extracted the Roboflow **source ID** from the file name and an **MD5** hash for duplicate / leakage audits.
- Computed per-image descriptors from a 128x128 grayscale view: brightness, contrast, foreground ratio, sharpness (Laplacian variance), entropy, chroma; plus a 32-bin intensity histogram, 32x32 thumbnails and class-mean images for later charts.
- Integer-encoded the target (`label_id`).

**Insights**
- The classes have very different *global* intensity statistics (mean brightness: glioma ~28, meningioma ~46, pituitary ~50, no tumor ~60; foreground coverage 0.41 / 0.51 / 0.66 / 0.61 respectively). This is partly anatomy/protocol, but it is also a **shortcut risk** that must be checked with explainability.
- All images are 640x640, so no cropping/padding logic is needed - only down-sizing for the network.

## ***4. Data Vizualization, Storytelling & Experimenting with charts : Understand the relationships between variables***

#### Chart - 1 Class distribution (Univariate) - interactive bar + donut

In [18]:
# Chart - 1 visualization code
# Chart - 1 : Class distribution (Univariate) - interactive bar + donut
counts = df.label.value_counts().reindex(CLASS_NAMES)
fig = make_subplots(rows=1, cols=2, specs=[[{"type": "xy"}, {"type": "domain"}]],
                    subplot_titles=("Images per class", "Share of dataset"))
fig.add_trace(go.Bar(x=counts.index, y=counts.values, marker_color=[CLASS_COLORS[c] for c in counts.index],
                     text=counts.values, textposition="outside", name="images"), 1, 1)
fig.add_trace(go.Pie(labels=counts.index, values=counts.values, hole=0.55, textinfo="label+percent",
                     marker=dict(colors=[CLASS_COLORS[c] for c in counts.index])), 1, 2)
fig.add_annotation(text=f"Imbalance<br><b>{counts.max() / counts.min():.2f} : 1</b>", x=0.82, y=0.5, showarrow=False)
fig.update_layout(title="Chart 1 - Class distribution", showlegend=False, height=430, yaxis_title="images")
fig.show()

##### 1. Why did you pick the specific chart?

Answer Here.

A **bar chart** gives exact counts per class and a **donut** shows each class's share; together they make imbalance obvious at a glance. Class balance is the first thing to check in any classification project because it determines the metric (macro-F1 over accuracy) and the need for class weights.

##### 2. What is/are the insight(s) found from the chart?

Answer Here

There are 2,443 images: glioma 805 (32.9 %), pituitary 610 (25.0 %), meningioma 545 (22.3 %) and no tumor 483 (19.8 %). The imbalance ratio is only **1.67 : 1** - mild, not severe. The healthy class is the smallest.

##### 3. Will the gained insights help creating a positive business impact?
Are there any insights that lead to negative growth? Justify with specific reason.

Answer Here

**Positive:** no resampling gymnastics are needed - inverse-frequency **class weights** are enough, and macro-averaged metrics keep the minority class visible. **Watch-out:** with the smallest class at ~20 %, a model could reach decent accuracy while under-serving 'no tumor'; in practice a missed tumor (false 'no tumor') is the costlier error, so recall per tumor class is monitored separately.

#### Chart - 2 Class mix per vendor split (Bivariate: categorical x categorical)

In [19]:
# Chart - 2 visualization code

# Chart - 2 : Class mix per vendor split (Bivariate: categorical x categorical)
ct = df.groupby(["original_split", "label"]).size().reset_index(name="images")
ct["pct_of_split"] = ct.images / ct.groupby("original_split").images.transform("sum") * 100
fig = px.bar(ct, x="original_split", y="images", color="label", barmode="group", color_discrete_map=CLASS_COLORS,
             text=ct.pct_of_split.round(1).astype(str) + "%", category_orders={"original_split": ["train", "valid", "test"], "label": CLASS_NAMES},
             title="Chart 2 - Images per class in each vendor split (labels show % of the split)")
fig.update_traces(textposition="outside"); fig.update_layout(height=450, xaxis_title="split")
fig.show()

##### 1. Why did you pick the specific chart?

Answer Here.

A **grouped bar chart** compares the same four classes across three splits side by side, which is the quickest way to see whether the vendor's split is stratified. Percentage labels remove the confusion caused by the splits having different sizes.

##### 2. What is/are the insight(s) found from the chart?

Answer Here

Class proportions are almost identical in every split (glioma ~33 %, pituitary ~25 %, meningioma ~22 %, no tumor ~20 %); the chi-square test in Section 5 gives p = 0.47. The **test set is small** (246 images, only 49 'no tumor').

##### 3. Will the gained insights help creating a positive business impact?
Are there any insights that lead to negative growth? Justify with specific reason.

Answer Here

**Positive:** the split is stratified, so train/validation behaviour should transfer to test. 

**Negative:** with 49 'no tumor' test images one error moves recall by ~2 pp, so single-split test metrics are noisy. That is why this project adds cross-validation and reports per-class metrics.

#### Chart - 3 Sample MRI gallery (visual inspection)


In [20]:
# Chart - 3 visualization code

# Chart - 3 : Sample MRI gallery (visual inspection)
montage_fig(df, n_per_class=5, size=240, title="Chart 3 - Five random MRI slices per class (hover for file name)").show()

##### 1. Why did you pick the specific chart?

Answer Here.

For image data the first 'chart' must be the images themselves. A **class x sample grid** reveals imaging planes, zoom, contrast, artefacts and label noise that no summary statistic can show.

##### 2. What is/are the insight(s) found from the chart?

Answer Here

The slices come from **different imaging planes and framings**, with a black background, large variation in zoom and brightness, and the tumors vary strongly in size and position. Despite the RGB format, the images are grayscale. No visible text overlays or corrupted images appear in the samples.

##### 3. Will the gained insights help creating a positive business impact?
Are there any insights that lead to negative growth? Justify with specific reason.

Answer Here

**Positive:** the variation argues for geometric/intensity **augmentation** and a CNN that learns spatial patterns rather than hand-crafted rules. **Negative:** because framing differs between classes (see Charts 10-13), a model may learn the framing instead of the tumor - hence Grad-CAM validation later.

#### Chart - 4 JPEG file-size distribution by class (Univariate, split by class)

In [21]:
# Chart - 4 visualization code

# Chart - 4 : JPEG file-size distribution by class (Univariate, split by class)
fig = px.histogram(df, x="file_kb", color="label", nbins=60, barmode="overlay", opacity=0.65, marginal="box",
                   color_discrete_map=CLASS_COLORS, category_orders={"label": CLASS_NAMES},
                   title="Chart 4 - File size (KB) distribution per class")
fig.update_layout(height=470, xaxis_title="file size (KB)")
fig.show()

##### 1. Why did you pick the specific chart?

Answer Here.

Compressed file size is a cheap proxy for image *complexity* (more edges/texture = larger JPEG). A **histogram with a marginal box plot** shows the shape, spread and outliers for each class at once.

##### 2. What is/are the insight(s) found from the chart?

Answer Here

Mean file size rises from glioma (~24 KB) to meningioma (~29 KB), pituitary (~36 KB) and no tumor (~40 KB). Distributions are right-skewed and the glioma and no-tumor curves barely overlap.

##### 3. Will the gained insights help creating a positive business impact?
Are there any insights that lead to negative growth? Justify with specific reason.

Answer Here

**Positive:** it shows the classes really differ in structure and a model has signal to learn. 

**Negative:** file size should never be a predictive signal; if a model separated classes by compression/acquisition differences it would fail on scans from other hospitals. This motivates group-aware evaluation and explainability.

#### Chart - 5

In [22]:
# Chart - 5 visualization code
# Chart - 5 : Mean brightness distribution per class (Univariate, split by class)
fig = px.histogram(df, x="brightness", color="label", nbins=70, barmode="overlay", opacity=0.65, marginal="rug",
                   color_discrete_map=CLASS_COLORS, category_orders={"label": CLASS_NAMES},
                   title="Chart 5 - Mean grayscale brightness (0-255) per class")
fig.update_layout(height=470)
fig.show()

##### 1. Why did you pick the specific chart?

Answer Here.

Brightness is the simplest global intensity feature. An **overlaid histogram** shows how well one number separates four classes and where classes overlap; the rug marks individual images.

##### 2. What is/are the insight(s) found from the chart?

Answer Here

Glioma images are dark and tightly clustered (mean ~28, sd ~6); no tumor is the brightest and widest (mean ~60, sd ~22); meningioma (~46) and pituitary (~50) overlap heavily with each other and with no tumor.

##### 3. Will the gained insights help creating a positive business impact?
Are there any insights that lead to negative growth? Justify with specific reason.

Answer Here

**Positive:** brightness alone already separates glioma from the rest, so the data is learnable and normalisation/contrast augmentation is well-motivated. 

**Negative:** it also exposes a **shortcut** a network could exploit; the overlap of the other three classes means fine spatial features are needed for them.

#### Chart - 6 Contrast (intensity std) by class (Bivariate: numerical x categorical)

In [23]:
# Chart - 6 visualization code

# Chart - 6 : Contrast (intensity std) by class (Bivariate: numerical x categorical)
fig = px.box(df, x="label", y="contrast", color="label", points="outliers", notched=True,
             color_discrete_map=CLASS_COLORS, category_orders={"label": CLASS_NAMES},
             title="Chart 6 - Image contrast (std of intensity) per class")
fig.update_layout(height=450, showlegend=False)
fig.show()

##### 1. Why did you pick the specific chart?

Answer Here.

A **notched box plot** compares medians, spread and outliers across categories; non-overlapping notches suggest the medians differ significantly - a visual preview of the hypothesis test.

##### 2. What is/are the insight(s) found from the chart?

Answer Here

Median contrast ordering: glioma (~34) < pituitary (~39) < meningioma (~47) < no tumor (~53). Glioma and pituitary are tight (sd ~5), while meningioma and especially no tumor are widely spread (sd ~10-14) with many high outliers.

##### 3. Will the gained insights help creating a positive business impact?
Are there any insights that lead to negative growth? Justify with specific reason.

Answer Here

**Positive:** the wide no-tumor spread means healthy scans come from varied acquisition settings - good for robustness *if* augmentation covers it.

 **Negative:** the heavy overlap between meningioma and no tumor predicts these two will be the most confusable pair for a weak model.

#### Chart - 7 Sharpness / texture (Laplacian variance) by class, log-scale (Bivariate)

In [24]:
# Chart - 7 visualization code

# Chart - 7 : Sharpness / texture (Laplacian variance) by class, log-scale (Bivariate)
fig = px.violin(df, x="label", y="sharpness", color="label", box=True, points=False, log_y=True,
                color_discrete_map=CLASS_COLORS, category_orders={"label": CLASS_NAMES},
                title="Chart 7 - Sharpness (variance of Laplacian) per class - log scale")
fig.update_layout(height=470, showlegend=False)
fig.show()

##### 1. Why did you pick the specific chart?

Answer Here.

Sharpness is heavily right-skewed, so a **violin on a log axis** shows the full distribution shape (not only quartiles) and keeps both low- and high-sharpness classes readable.

##### 2. What is/are the insight(s) found from the chart?

Answer Here

No tumor has the highest typical sharpness (mean ~1,440), about **3x glioma** (~440); meningioma (~650) and pituitary (~770) sit between. Each class spans more than an order of magnitude.

##### 3. Will the gained insights help creating a positive business impact?
Are there any insights that lead to negative growth? Justify with specific reason.

Answer Here

**Positive:** texture/edge detail differs by class, supporting convolutional feature learning. 

**Negative:** sharpness depends on scanner, resolution and compression, so it must not be a decision basis; we keep input resolution fixed and rely on augmentation + Grad-CAM to avoid reliance on it.

#### Chart - 8 Brightness vs contrast (Bivariate: numerical x numerical) with marginals

In [25]:
# Chart - 8 visualization code

# Chart - 8 : Brightness vs contrast (Bivariate: numerical x numerical) with marginals
sample = df.sample(min(len(df), 1800), random_state=SEED)
fig = px.scatter(sample, x="brightness", y="contrast", color="label", opacity=0.65, marginal_x="box", marginal_y="violin",
                 color_discrete_map=CLASS_COLORS, category_orders={"label": CLASS_NAMES}, hover_data=["filename", "fg_ratio"],
                 title="Chart 8 - Brightness vs contrast (interactive; hover for file name)")
fig.update_layout(height=560)
fig.show()

##### 1. Why did you pick the specific chart?

Answer Here.

A **scatter plot with marginal distributions** is the standard way to inspect two continuous variables jointly; colouring by class shows whether a simple 2-D boundary exists.

##### 2. What is/are the insight(s) found from the chart?

Answer Here

Glioma forms a compact cluster in the low-brightness / low-contrast corner. Brightness and contrast are positively related (r ~ 0.7). No tumor spreads over the upper-right region and overlaps with meningioma and pituitary in the centre.

##### 3. Will the gained insights help creating a positive business impact?
Are there any insights that lead to negative growth? Justify with specific reason.

Answer Here

**Positive:** a coarse boundary exists, so even simple baselines work (see the metadata baseline in Section 6.4) - the CNN must beat it by learning anatomy.

 **Negative:** the overlapping centre is where errors will concentrate; those are the cases that should be flagged for human review.

#### Chart - 9 Data-leakage audit - source scans shared across vendor splits (Bivariate: cat x cat)

In [26]:
# Chart - 9 visualization code

# Chart - 9 : Data-leakage audit - source scans shared across vendor splits (Bivariate: cat x cat)
combo = df.groupby("source_id").original_split.agg(lambda s: " + ".join(sorted(set(s))))
n_img = df.groupby("source_id").size()
leak = (pd.DataFrame({"combo": combo, "images": n_img}).groupby("combo")
        .agg(source_scans=("images", "size"), images=("images", "sum")).reset_index())
leak["status"] = np.where(leak.combo.str.contains(r"\+"), "LEAKAGE (spans splits)", "clean")
df["leaked_sibling"] = df.groupby("source_id").original_split.transform("nunique") > 1
per_split = df.groupby("original_split").leaked_sibling.mean().reindex(["train", "valid", "test"]) * 100

fig = make_subplots(rows=1, cols=2, column_widths=[0.6, 0.4],
                    subplot_titles=("Source scans by the split(s) they appear in", "% of each split's images that have a sibling in another split"))
for status, colr in [("clean", "#76B041"), ("LEAKAGE (spans splits)", "#E4572E")]:
    s = leak[leak.status == status]
    fig.add_trace(go.Bar(x=s.combo, y=s.source_scans, name=status, marker_color=colr, text=s.source_scans, textposition="outside"), 1, 1)
fig.add_trace(go.Bar(x=per_split.index, y=per_split.values, marker_color="#E4572E", showlegend=False,
                     text=per_split.round(1).astype(str) + "%", textposition="outside"), 1, 2)
fig.update_yaxes(title_text="source scans", row=1, col=1); fig.update_yaxes(title_text="% images", row=1, col=2)
fig.update_layout(title="Chart 9 - Leakage audit using Roboflow source IDs", height=480, legend=dict(orientation="h", y=-0.2))
fig.show()

print(
    f"{int(combo.str.contains('+', regex=False).sum())} of {len(combo)} "
    f"source scans appear in more than one split; "
    f"{int(df['leaked_sibling'].sum())} images affected."
)


164 of 2091 source scans appear in more than one split; 328 images affected.


##### 1. Why did you pick the specific chart?

Answer Here.

This is a **domain-specific audit chart**, not a generic one: it counts each source scan by the splits it appears in. Bars make the number of 'leaking' groups visible, and the second panel translates it into the share of each split that is contaminated - the number that really matters.

##### 2. What is/are the insight(s) found from the chart?

Answer Here

2,443 images come from only **2,091 source scans** (352 scans have two augmented copies). **164 source IDs occur in more than one split** (97 train+valid, 57 train+test, 10 valid+test) - **328 images** are involved, including **67 of the 246 test images (27 %)**.

##### 3. Will the gained insights help creating a positive business impact?
Are there any insights that lead to negative growth? Justify with specific reason.

Answer Here

**Positive:** finding this *before* modelling prevents a classic, recruiter-visible mistake - inflated test accuracy from near-duplicate leakage. The project re-splits **by source ID** (Section 6.8) and asserts zero overlap. 

**Negative (if ignored):** reported accuracy would look better than real-world performance, an unacceptable risk for a medical use case.

#### Chart - 10 Average intensity histogram per class (Multivariate profile) - toggle log/linear axis

In [27]:
# Chart - 10 visualization code

# Chart - 10 : Average intensity histogram per class (Multivariate profile) - toggle log/linear axis
bin_centers = np.linspace(0, 255, 33)[:-1] + 255 / 64
fig = go.Figure()
for c in CLASS_NAMES:
    fig.add_trace(go.Scatter(x=bin_centers, y=HIST32[(df.label == c).values].mean(0), mode="lines", name=c, fill="tozeroy",
                             line=dict(color=CLASS_COLORS[c], width=2), opacity=0.55))
fig.update_layout(title="Chart 10 - Mean pixel-intensity histogram per class", xaxis_title="grayscale intensity (0-255)",
                  yaxis_title="share of pixels", yaxis_type="log", height=480,
                  updatemenus=[dict(type="buttons", direction="right", x=0.6, y=1.15,
                                    buttons=[dict(label="log y", method="relayout", args=[{"yaxis.type": "log"}]),
                                             dict(label="linear y", method="relayout", args=[{"yaxis.type": "linear"}])])])
fig.show()

##### 1. Why did you pick the specific chart?

Answer Here.

A **line/area profile of the average intensity histogram** compares the whole intensity distribution of each class, not just its mean. The log/linear toggle makes both the huge black-background spike and the tissue range readable.

##### 2. What is/are the insight(s) found from the chart?

Answer Here

All classes have a giant spike in the darkest bin (background). Glioma has the largest share of near-black pixels, while pituitary and no tumor shift more mass into the mid-to-bright tissue range.

##### 3. Will the gained insights help creating a positive business impact?
Are there any insights that lead to negative growth? Justify with specific reason.

Answer Here

**Positive:** it justifies pixel scaling to [0, 1] / [-1, 1] and highlights that the background carries no pathology. 

**Negative:** class-specific background fractions again show a shortcut opportunity - random zoom/translation augmentation reduces it by breaking fixed framing.

#### Chart - 11

In [28]:
# Chart - 11 visualization code

# Chart - 11 : Class-mean MRI (Multivariate: spatial average of all images in a class)
stack = np.stack([MEAN_IMAGES[c] for c in CLASS_NAMES])
fig = px.imshow(stack, facet_col=0, facet_col_wrap=4, color_continuous_scale="gray", zmin=0, zmax=float(stack.max()),
                title="Chart 11 - Average MRI per class (where is the signal located on average?)")
for i, ann in enumerate(fig.layout.annotations):
    ann.text = CLASS_NAMES[i]
fig.update_layout(height=430, coloraxis_showscale=True)
fig.update_xaxes(visible=False); fig.update_yaxes(visible=False)
fig.show()

##### 1. Why did you pick the specific chart?

Answer Here.

Averaging every image of a class highlights **where bright tissue typically is** and how consistent the framing is. It is a quick way to see whether position/shape differences are systematic.

##### 2. What is/are the insight(s) found from the chart?

Answer Here

The class-mean images look like blurry head outlines with different overall brightness and spread - glioma is dimmest and most compact, while pituitary and no-tumor fill more of the frame. The lack of a sharp, tumor-shaped blob shows that tumor *location varies widely* between scans.

##### 3. Will the gained insights help creating a positive business impact?
Are there any insights that lead to negative growth? Justify with specific reason.

Answer Here

**Positive:** no single fixed region identifies a class, so a CNN with spatial invariance (convolution + pooling) is appropriate. 

**Negative:** systematic differences in framing/brightness are exactly what Grad-CAM must rule out as the model's real reason for predicting a class.

#### Chart - 12 Brain foreground coverage by class (Bivariate)

In [29]:
# Chart - 12 visualization code

# Chart - 12 : Brain foreground coverage by class (Bivariate)
fig = px.box(df, x="label", y="fg_ratio", color="label", points="all", color_discrete_map=CLASS_COLORS,
             category_orders={"label": CLASS_NAMES}, hover_data=["filename"],
             title="Chart 12 - Share of non-background pixels (intensity > 20) per class")
fig.update_traces(marker=dict(size=3, opacity=0.35)); fig.update_layout(height=470, showlegend=False)
fig.show()

##### 1. Why did you pick the specific chart?

Answer Here.

`fg_ratio` measures how much of the frame is head/brain rather than black background. A **box plot with all points** shows the median, IQR and every individual image, which matters because the classes overlap.

##### 2. What is/are the insight(s) found from the chart?

Answer Here

Mean foreground coverage rises from glioma (~0.41) through meningioma (~0.51) and no tumor (~0.61) to pituitary (~0.66). The ranges overlap for the three non-glioma classes.

##### 3. Will the gained insights help creating a positive business impact?
Are there any insights that lead to negative growth? Justify with specific reason.

Answer Here

**Positive:** shows that images are not cropped uniformly, supporting zoom/translation augmentation and resizing without aspect-ratio change.

 **Negative:** if a model leaned on coverage it would fail on scans cropped differently; one more reason to review Grad-CAM heatmaps.

#### Chart - 13 Class composition by brightness quartile (Bivariate: cat x cat, 100 % stacked)

In [30]:
# Chart - 13 visualization code

# Chart - 13 : Class composition by brightness quartile (Bivariate: cat x cat, 100 % stacked)
df["brightness_quartile"] = pd.qcut(df.brightness, 4, labels=["Q1 darkest", "Q2", "Q3", "Q4 brightest"])
mix = (pd.crosstab(df.brightness_quartile, df.label, normalize="index") * 100).reset_index().melt(id_vars="brightness_quartile", value_name="percent")
fig = px.bar(mix, x="brightness_quartile", y="percent", color="label", color_discrete_map=CLASS_COLORS,
             category_orders={"label": CLASS_NAMES}, text=mix.percent.round(1), title="Chart 13 - Class mix inside each brightness quartile")
fig.update_traces(textposition="inside"); fig.update_layout(height=470, yaxis_title="% of images in quartile")
fig.show()

##### 1. Why did you pick the specific chart?

Answer Here.

Binning a numeric feature into **quartiles and stacking class shares** translates a distribution plot into a direct 'if the image is this bright, which class is it?' view that business readers understand immediately.

##### 2. What is/are the insight(s) found from the chart?

Answer Here

The darkest quartile is **90.5 % glioma**; the brightest quartile is 46.3 % no tumor, 35.5 % pituitary, 17.7 % meningioma and only 0.5 % glioma. Meningioma peaks in the middle quartiles.

##### 3. Will the gained insights help creating a positive business impact?
Are there any insights that lead to negative growth? Justify with specific reason.

Answer Here

**Positive:** a single global statistic already carries a lot of class information, so a CNN will converge fast.

 **Negative:** it quantifies the shortcut risk - the project later trains a *metadata-only* model (about 83 % accuracy with six crude statistics) and uses it as a bar that the deep models must clearly beat, and verifies attention with Grad-CAM.

#### Chart - 14 - Correlation Heatmap (Multivariate)

In [31]:
# Correlation Heatmap visualization code

# Chart - 14 : Correlation heatmap (Multivariate)
corr = df[FEATURES].corr()
fig = px.imshow(corr, text_auto=".2f", color_continuous_scale="RdBu_r", zmin=-1, zmax=1, aspect="auto",
                title="Chart 14 - Correlation heatmap of image descriptors")
fig.update_layout(height=520)
fig.show()

##### 1. Why did you pick the specific chart?

Answer Here.

A **correlation heatmap** is the standard multivariate check for redundant features and multicollinearity; the diverging colour scale makes strong positive/negative relations pop out.

##### 2. What is/are the insight(s) found from the chart?

Answer Here

Brightness, foreground ratio, entropy and file size are strongly correlated (r ~ 0.73-0.86, e.g. fg_ratio-entropy 0.86, brightness-fg_ratio 0.82); contrast is only moderately related to foreground coverage (0.28). Sharpness correlates mostly with file size (0.80).

#### Chart - 15 - Pair Plot (Multivariate) - interactive scatter matrix

In [85]:
# Pair Plot visualization code

# Chart - 15 : Pair plot (Multivariate) - interactive scatter matrix
dims = ["brightness", "contrast", "fg_ratio", "sharpness", "entropy"]
sm = df.sample(min(len(df), 1200), random_state=SEED)
fig = px.scatter_matrix(sm, dimensions=dims, color="label", color_discrete_map=CLASS_COLORS,
                        category_orders={"label": CLASS_NAMES}, opacity=0.55,
                        title="Chart 15 - Pair plot of image descriptors (1,200-image sample)")
fig.update_traces(diagonal_visible=False, showupperhalf=False, marker=dict(size=3))
fig.update_layout(height=780)
fig.show()

##### 1. Why did you pick the specific chart?

Answer Here.

A **pair plot** shows every pairwise relationship at once, coloured by class, and answers the multivariate question: can any combination of simple descriptors separate the four classes?

##### 2. What is/are the insight(s) found from the chart?

Answer Here

Glioma separates cleanly in most panels; pituitary separates partially on foreground ratio/entropy; meningioma and no tumor overlap strongly in all panels. Sharpness is skewed and benefits from a log transform.

## ***5. Hypothesis Testing***

### Based on your chart experiments, define three hypothetical statements from the dataset. In the next three questions, perform hypothesis testing to obtain final conclusion about the statements through your code and statistical testing.

Answer Here.

Three statements were derived from the charts. All tests use a significance level of **alpha = 0.05**.

1. **H1 (Chart 5):** mean brightness differs between tumor classes.
2. **H2 (Charts 6 and 8):** image contrast differs between tumor classes.
3. **H3 (Chart 2):** class proportions are the same in the vendor's train / valid / test splits (a stratification check that determines whether test metrics are comparable).

### Hypothetical Statement - 1

#### 1. State Your research hypothesis as a null hypothesis and alternate hypothesis.

Answer Here.

- **H0:** The distribution (median) of image brightness is the same for all four classes.
- **H1 (alternative):** At least one class has a different brightness distribution.

#### 2. Perform an appropriate statistical test.

In [33]:
# Perform Statistical Test to obtain P-Value

# Hypothesis 1 - Kruskal-Wallis H-test on brightness across the four classes
def decision(p, alpha=0.05):
    return "REJECT H0 (significant difference)" if p < alpha else "FAIL TO REJECT H0 (no significant difference)"

groups = [g["brightness"].astype(float).values for _, g in df.groupby("label")]
H, p1 = stats.kruskal(*groups)
eps2 = H / (len(df) - 1)                      # epsilon-squared effect size
print(f"Kruskal-Wallis H = {H:.1f}, p-value = {p1:.3e}, epsilon^2 = {eps2:.3f}  ->  {decision(p1)}")

# Post-hoc: pairwise Mann-Whitney U with Bonferroni correction
pairs, rows_ = [(a, b) for i, a in enumerate(CLASS_NAMES) for b in CLASS_NAMES[i + 1:]], []
for a, b in pairs:
    u, pp = stats.mannwhitneyu(df.loc[df.label == a, "brightness"], df.loc[df.label == b, "brightness"])
    rows_.append(dict(pair=f"{a} vs {b}", U=u, p_bonferroni=min(1.0, pp * len(pairs))))
display(pd.DataFrame(rows_).round(6))

Kruskal-Wallis H = 1415.5, p-value = 1.299e-306, epsilon^2 = 0.580  ->  REJECT H0 (significant difference)


,pair,U,p_bonferroni
0,glioma vs meningioma,42467.0,0.0
1,glioma vs no_tumor,18002.0,0.0
2,glioma vs pituitary,10676.0,0.0
3,meningioma vs no_tumor,74129.0,0.0
4,meningioma vs pituitary,95443.0,0.0
5,no_tumor vs pituitary,184271.5,0.0


##### Which statistical test have you done to obtain P-Value?

Answer Here.

**Kruskal-Wallis H-test** (non-parametric one-way ANOVA on ranks) with a Bonferroni-corrected pairwise Mann-Whitney U post-hoc.

##### Why did you choose the specific statistical test?

Answer Here.

We compare **more than two independent groups** on a continuous variable. Chart 5 shows skewed, non-normal brightness distributions with different spreads, so the rank-based Kruskal-Wallis test is safer than ANOVA. The post-hoc test tells us *which* class pairs differ, and Bonferroni controls the family-wise error rate. **Conclusion:** H0 is rejected (p far below 0.05) and the effect is large - brightness differs strongly between classes, confirming the shortcut risk.

### Hypothetical Statement - 2

#### 1. State Your research hypothesis as a null hypothesis and alternate hypothesis.

Answer Here.

- **H0:** Mean contrast (intensity standard deviation) is equal across the four classes.
- **H1 (alternative):** At least one class has a different mean contrast.

#### 2. Perform an appropriate statistical test.

In [34]:
# Perform Statistical Test to obtain P-Value

# Hypothesis 2 - Levene (equal variances?) then Welch/one-way ANOVA + Tukey HSD on contrast
cgroups = [g["contrast"].astype(float).values for _, g in df.groupby("label")]
lev_stat, lev_p = stats.levene(*cgroups)
F, p2 = stats.f_oneway(*cgroups)
grand = df.contrast.astype(float).mean()
eta2 = sum(len(g) * (g.mean() - grand) ** 2 for g in cgroups) / ((df.contrast.astype(float) - grand) ** 2).sum()
print(f"Levene W = {lev_stat:.1f}, p = {lev_p:.2e}  (unequal variances -> interpret ANOVA with care)")
print(f"One-way ANOVA F = {F:.1f}, p-value = {p2:.3e}, eta^2 = {eta2:.3f}  ->  {decision(p2)}")
try:
    tk = stats.tukey_hsd(*cgroups)
    display(pd.DataFrame(tk.pvalue, index=CLASS_NAMES, columns=CLASS_NAMES).round(4).rename_axis("Tukey HSD p-values"))
except Exception as e:                                           # older SciPy
    print("Tukey HSD not available:", e)

Levene W = 203.7, p = 7.05e-118  (unequal variances -> interpret ANOVA with care)
One-way ANOVA F = 567.2, p-value = 1.252e-279, eta^2 = 0.411  ->  REJECT H0 (significant difference)


,glioma,meningioma,no_tumor,pituitary
Tukey HSD p-values,,,,
glioma,1.0,0.0,0.0,0.0
meningioma,0.0,1.0,0.0,0.0
no_tumor,0.0,0.0,1.0,0.0
pituitary,0.0,0.0,0.0,1.0


##### Which statistical test have you done to obtain P-Value?

Answer Here.

**One-way ANOVA (F-test)** after a Levene test for equal variances, followed by **Tukey HSD** post-hoc comparisons.

##### Why did you choose the specific statistical test?

Answer Here.

Contrast is a continuous variable and we compare four independent groups. With n = 2,443 the ANOVA is robust to moderate non-normality (central limit theorem); Levene's test shows the variances differ, so the result is read together with the effect size (eta-squared) and the non-parametric result from H1. Tukey HSD identifies which pairs differ. **Conclusion:** H0 is rejected - contrast differs significantly across classes.

### Hypothetical Statement - 3

#### 1. State Your research hypothesis as a null hypothesis and alternate hypothesis.

Answer Here.

- **H0:** Class proportions are independent of the vendor split (train / valid / test are identically stratified).
- **H1 (alternative):** Class proportions depend on the split.

#### 2. Perform an appropriate statistical test.

In [35]:
# Perform Statistical Test to obtain P-Value

# Hypothesis 3 - Chi-square test of independence: vendor split x class
ct = pd.crosstab(df.original_split, df.label)
chi2, p3, dof, _ = stats.chi2_contingency(ct)
cramers_v = np.sqrt(chi2 / (ct.values.sum() * (min(ct.shape) - 1)))
print(f"chi2 = {chi2:.2f}, dof = {dof}, p-value = {p3:.3f}, Cramer's V = {cramers_v:.3f}  ->  {decision(p3)}")
display(ct)

chi2 = 5.59, dof = 6, p-value = 0.470, Cramer's V = 0.034  ->  FAIL TO REJECT H0 (no significant difference)


label,glioma,meningioma,no_tumor,pituitary
original_split,,,,
test,80,63,49,54
train,564,358,335,438
valid,161,124,99,118


##### Which statistical test have you done to obtain P-Value?

Answer Here.

**Chi-square test of independence** (with Cramer's V as effect size).

##### Why did you choose the specific statistical test?

Answer Here.

Both variables are **categorical** and the data are counts in a contingency table with all expected counts well above 5, which are the conditions for the chi-square test. **Conclusion (full data):** p is about 0.47 so we fail to reject H0 - the vendor splits are consistently stratified. That is good news for comparability, but it says nothing about *leakage* (shared source scans), which is handled by the group-aware re-split.

## ***6. Feature Engineering & Data Pre-processing***

### 1. Handling Missing Values

In [36]:
# Handling Missing Values & Missing Value Imputation

# Handling Missing Values -> for images: integrity audit (corrupt / unreadable / wrong-mode files)
bad_files = []
for p in df.path:
    try:
        with Image.open(p) as im:
            im.verify()                         # cheap structural check without full decoding
    except Exception as e:
        bad_files.append((p, str(e)))
print(f"Unreadable / corrupt images: {len(bad_files)}")
print("Colour modes found:", df["mode"].value_counts().to_dict())
print(f"Max mean |R-G| difference: {df.chroma.max():.2f} (0 = pure grayscale)")
if bad_files:                                   # production-grade: drop them instead of crashing later
    keep = ~df.path.isin([b[0] for b in bad_files]).values
    df = df[keep].reset_index(drop=True)
    HIST32, THUMBS = HIST32[keep], THUMBS[keep]          # keep the per-image arrays aligned with df
    print("Removed corrupt files ->", len(df), "images remain")
else:
    print("No imputation or removal needed - the dataset is complete and clean.")

Unreadable / corrupt images: 0
Colour modes found: {'RGB': 2443}
Max mean |R-G| difference: 1.91 (0 = pure grayscale)
No imputation or removal needed - the dataset is complete and clean.


#### What all missing value imputation techniques have you used and why did you use those techniques?

Answer Here.

There were **no missing metadata values and no corrupt images**, so no imputation was required. Instead of imputing, the cell above is a defensive **integrity audit** (structural verification of every JPEG; automatic removal if one fails) so the notebook stays executable in one go on any copy of the dataset. For images, 'missing data' would mean unreadable pixels - which would be dropped, not imputed, because inventing medical pixels is unsafe.

### 2. Handling Outliers

In [37]:
# Handling Outliers & Outlier treatments

# Handling Outliers -> flag extreme images with the IQR rule per class (flag, inspect, but keep)
def iqr_flags(s):
    q1, q3 = s.quantile([0.25, 0.75]); iqr = q3 - q1
    return (s < q1 - 1.5 * iqr) | (s > q3 + 1.5 * iqr)

for col in ["brightness", "sharpness", "fg_ratio"]:
    df[f"out_{col}"] = df.groupby("label")[col].transform(iqr_flags)
df["is_outlier"] = df[["out_brightness", "out_sharpness", "out_fg_ratio"]].any(axis=1)
summary = df.groupby("label")[["out_brightness", "out_sharpness", "out_fg_ratio", "is_outlier"]].sum()
display(summary)
print(f"{int(df.is_outlier.sum())} images ({df.is_outlier.mean():.1%}) flagged on at least one descriptor - none removed.")

fig = px.bar(summary.reset_index().melt(id_vars="label", var_name="rule", value_name="images"), x="label", y="images",
             color="rule", barmode="group", title="Outlier flags per class and descriptor (IQR rule)")
fig.update_layout(height=420); fig.show()
extreme = df[df.is_outlier].assign(z=lambda d: (d.brightness - d.groupby("label").brightness.transform("mean")).abs()).nlargest(5, "z")
montage_fig(extreme.assign(label="most extreme"), n_per_class=min(5, len(extreme)), size=200,
            title="The 5 most extreme-brightness images (kept in the data)").show()

,out_brightness,out_sharpness,out_fg_ratio,is_outlier
label,,,,
glioma,23,0,21,32
meningioma,70,49,22,81
no_tumor,5,23,0,27
pituitary,15,8,13,21


161 images (6.6%) flagged on at least one descriptor - none removed.


##### What all outlier treatment techniques have you used and why did you use those techniques?

Answer Here.

**IQR rule per class** (Q1 - 1.5 IQR, Q3 + 1.5 IQR) on brightness, sharpness and foreground ratio. Outliers were **flagged and visually inspected but not removed**: in medical imaging an unusual scan (different protocol, zoom or pathology size) is *clinically legitimate variation*, and a deployed model will meet such cases. Removing them would make the test score look better but the model more fragile. Robustness is instead obtained through augmentation (brightness/contrast/zoom), normalisation and BatchNorm.

### 3. Categorical Encoding

In [38]:
# Encode your categorical columns

# Encode categorical columns -> integer labels (sparse categorical cross-entropy) + one-hot view
LABEL2ID = {c: i for i, c in enumerate(CLASS_NAMES)}
ID2LABEL = {i: c for c, i in LABEL2ID.items()}
df["label_id"] = df.label.map(LABEL2ID)
print("Label mapping:", LABEL2ID)
display(pd.concat([df[["label", "label_id"]].head(5).reset_index(drop=True),
                   pd.get_dummies(df.label).astype(int).head(5).reset_index(drop=True).add_prefix("onehot_")], axis=1))

Label mapping: {'glioma': 0, 'meningioma': 1, 'no_tumor': 2, 'pituitary': 3}


,label,label_id,onehot_glioma,onehot_meningioma,onehot_no_tumor,onehot_pituitary
0,glioma,0,1,0,0,0
1,glioma,0,1,0,0,0
2,glioma,0,1,0,0,0
3,glioma,0,1,0,0,0
4,glioma,0,1,0,0,0


#### What all categorical encoding techniques have you used & why did you use those techniques?

Answer Here.

**Integer (label) encoding** of the target, used with `sparse_categorical_crossentropy` - it is memory-efficient and equivalent to one-hot encoding with categorical cross-entropy (a one-hot view is shown for reference). The four classes are nominal, so no ordinal meaning is implied; the network's softmax output layer treats them independently. No other categorical predictors exist: the model input is the image itself.

### 4. Textual Data Preprocessing
(It's mandatory for textual dataset i.e., NLP, Sentiment Analysis, Text Clustering etc.)

*This is an image-classification project, so the data contains no text column. The cells below demonstrate the standard text-preprocessing steps on a few made-up MRI-report snippets. They are self-contained (pure Python, no downloads) and never modify the image DataFrame `df`.*

In [39]:
# Text preprocessing helpers (self-contained demo - does not touch the image DataFrame `df`)
import re

# Common English contractions
CONTRACTIONS = {
    "ain't": "is not",
    "aren't": "are not",
    "can't": "cannot",
    "couldn't": "could not",
    "didn't": "did not",
    "doesn't": "does not",
    "don't": "do not",
    "hadn't": "had not",
    "hasn't": "has not",
    "haven't": "have not",
    "he'd": "he would",
    "he'll": "he will",
    "he's": "he is",
    "i'd": "i would",
    "i'll": "i will",
    "i'm": "i am",
    "i've": "i have",
    "isn't": "is not",
    "it's": "it is",
    "let's": "let us",
    "mustn't": "must not",
    "shan't": "shall not",
    "she'd": "she would",
    "she'll": "she will",
    "she's": "she is",
    "shouldn't": "should not",
    "that's": "that is",
    "there's": "there is",
    "they'd": "they would",
    "they'll": "they will",
    "they're": "they are",
    "they've": "they have",
    "wasn't": "was not",
    "we're": "we are",
    "weren't": "were not",
    "we've": "we have",
    "won't": "will not",
    "wouldn't": "would not",
    "you're": "you are",
    "you've": "you have"
}


def expand_contractions(text):
    """Expand common English contractions."""
    if not isinstance(text, str):
        return ""

    text = text.lower()

    for contraction, expansion in CONTRACTIONS.items():
        pattern = r"\b" + re.escape(contraction) + r"\b"
        text = re.sub(pattern, expansion, text)

    return text


def standardize_text(text):
    """Standardize text for NLP processing."""
    if not isinstance(text, str):
        return ""

    # 1. Expand contractions
    text = expand_contractions(text)

    # 2. Remove URLs
    text = re.sub(r"https?://\S+|www\.\S+", " ", text)

    # 3. Remove HTML tags
    text = re.sub(r"<[^>]+>", " ", text)

    # 4. Remove special characters and digits
    # Preserve letters and whitespace
    text = re.sub(r"[^a-z\s]", " ", text)

    # 5. Normalize whitespace
    text = re.sub(r"\s+", " ", text).strip()

    return text

# Demo on made-up report snippets
sample_texts = [
    "The MRI scan doesn't show a tumor.",
    "The patient can't attend today's appointment.",
    "The report isn't available at https://example.com/report",
    "The scan is NORMAL!!!"
]

for original in sample_texts:
    processed = standardize_text(original)

    print("Original :", original)
    print("Processed:", processed)
    print("-" * 60)

Original : The MRI scan doesn't show a tumor.
Processed: the mri scan does not show a tumor
------------------------------------------------------------
Original : The patient can't attend today's appointment.
Processed: the patient cannot attend today s appointment
------------------------------------------------------------
Original : The report isn't available at https://example.com/report
Processed: the report is not available at
------------------------------------------------------------
Original : The scan is NORMAL!!!
Processed: the scan is normal
------------------------------------------------------------


#### 1. Expand Contraction

In [40]:
# Expand Contraction


import re

# Dictionary of common English contractions
CONTRACTIONS = {
    "aren't": "are not",
    "can't": "cannot",
    "couldn't": "could not",
    "didn't": "did not",
    "doesn't": "does not",
    "don't": "do not",
    "hadn't": "had not",
    "hasn't": "has not",
    "haven't": "have not",
    "isn't": "is not",
    "it's": "it is",
    "shouldn't": "should not",
    "wasn't": "was not",
    "weren't": "were not",
    "won't": "will not",
    "wouldn't": "would not",
    "I'm": "I am",
    "I've": "I have",
    "we're": "we are",
    "they're": "they are",
    "you're": "you are"
}

def expand_contractions(text):
    """Expand contractions in a text string."""
    if not isinstance(text, str):
        return ""

    pattern = re.compile(
        r"\b(" + "|".join(
            re.escape(key) for key in
            sorted(CONTRACTIONS, key=len, reverse=True)
        ) + r")\b",
        flags=re.IGNORECASE
    )

    def replace(match):
        contraction = match.group(0)
        expansion = CONTRACTIONS.get(
            contraction,
            CONTRACTIONS.get(contraction.lower())
        )
        return expansion if expansion else contraction

    return pattern.sub(replace, text)


# Example
text = "The MRI scan doesn't show a tumor, and it isn't abnormal."

processed_text = expand_contractions(text)

print("Original Text :", text)
print("Expanded Text:", processed_text)

Original Text : The MRI scan doesn't show a tumor, and it isn't abnormal.
Expanded Text: The MRI scan does not show a tumor, and it is not abnormal.


#### 2. Lower Casing

In [41]:
# Lower Casing

# Step 2: Lower Casing

def convert_to_lowercase(text):
    """Convert text to lowercase."""
    if not isinstance(text, str):
        return ""

    return text.lower()


# Example
text = "BRAIN MRI SCAN SHOWS Glioma Tumor Classification."

processed_text = convert_to_lowercase(text)

print("Original Text :", text)
print("Lowercase Text:", processed_text)

Original Text : BRAIN MRI SCAN SHOWS Glioma Tumor Classification.
Lowercase Text: brain mri scan shows glioma tumor classification.


#### 3. Removing Punctuations

In [42]:
# Remove Punctuations

import string

# Step 3: Removing Punctuations

def remove_punctuation(text):
    """Remove punctuation marks from text."""
    if not isinstance(text, str):
        return ""

    translator = str.maketrans("", "", string.punctuation)
    return text.translate(translator)


# Example
text = "Brain MRI scan: tumor detected! Is it malignant?"

processed_text = remove_punctuation(text)

print("Original Text    :", text)
print("Without Punctuation:", processed_text)

Original Text    : Brain MRI scan: tumor detected! Is it malignant?
Without Punctuation: Brain MRI scan tumor detected Is it malignant


#### 4. Removing URLs & Removing words and digits contain digits.

In [43]:
# Remove URLs & Remove words and digits contain digits

import re

# Step 4A: Removing URLs
def remove_urls(text):
    """Remove URLs from text."""
    if not isinstance(text, str):
        return ""

    url_pattern = r"https?://\S+|www\.\S+"
    return re.sub(url_pattern, "", text)


# Step 4B: Removing Words Containing Digits
def remove_words_with_digits(text):
    """Remove words containing one or more digits."""
    if not isinstance(text, str):
        return ""

    # Remove tokens containing numeric digits
    return re.sub(r"\b\w*\d+\w*\b", "", text)


# Combined preprocessing
def clean_text(text):
    text = remove_urls(text)
    text = remove_words_with_digits(text)
    text = re.sub(r"\s+", " ", text).strip()
    return text


# Example
text = (
    "MRI scan 2026 shows tumor in patient A123. "
    "Visit https://example.com/report for details. "
    "The T2-weighted image was captured."
)

processed_text = clean_text(text)

print("Original Text :", text)
print("Cleaned Text  :", processed_text)

Original Text : MRI scan 2026 shows tumor in patient A123. Visit https://example.com/report for details. The T2-weighted image was captured.
Cleaned Text  : MRI scan shows tumor in patient . Visit for details. The -weighted image was captured.


#### 5. Removing Stopwords & Removing White spaces

In [44]:
# Remove Stopwords
import re

try:                                     # use the NLTK stop-word list when it can be loaded ...
    import nltk
    from nltk.corpus import stopwords
    nltk.download("stopwords", quiet=True)
    STOP_WORDS = set(stopwords.words("english"))
except Exception:                        # ... otherwise fall back to a built-in list (works offline)
    STOP_WORDS = {"a", "an", "the", "and", "or", "but", "if", "in", "on", "at", "to", "of", "for", "with", "by",
                  "from", "is", "are", "was", "were", "be", "been", "being", "it", "this", "that", "these",
                  "those", "as", "there", "their", "its", "into", "than", "then", "so", "such", "no", "not"}

# Step 5A: Removing Stopwords
def remove_stopwords(text):
    """Remove English stopwords from text."""
    if not isinstance(text, str):
        return ""

    tokens = re.findall(r"\w+|[^\w\s]", text)          # simple word / punctuation tokenizer
    return " ".join(word for word in tokens if word.lower() not in STOP_WORDS)


# Example
text = "The MRI scan is showing a tumor in the brain."

processed_text = remove_stopwords(text)

print("Original Text :", text)
print("Without Stopwords:", processed_text)

Original Text : The MRI scan is showing a tumor in the brain.
Without Stopwords: MRI scan showing tumor brain .


In [45]:
# Remove White spaces


import re

# Step 6: Removing White Spaces
def remove_whitespace(text):
    """Normalize whitespace in text."""
    if not isinstance(text, str):
        return ""

    # Replace multiple whitespace characters with one space
    text = re.sub(r"\s+", " ", text)

    # Remove leading and trailing spaces
    return text.strip()


# Example
text = "   Brain   MRI    scan   shows   tumor.   "

processed_text = remove_whitespace(text)

print("Original Text :", repr(text))
print("Cleaned Text  :", repr(processed_text))

Original Text : '   Brain   MRI    scan   shows   tumor.   '
Cleaned Text  : 'Brain MRI scan shows tumor.'


#### 6. Rephrase Text

In [46]:
# Rephrase Text


import re

def rephrase_text(text):
    """Apply simple, predefined phrase replacements."""
    if not isinstance(text, str):
        return ""

    replacements = {
        r"\bshows\b": "indicates",
        r"\bdetected\b": "identified",
        r"\bdoctor\b": "physician",
        r"\bscan\b": "imaging examination",
        r"\bnormal\b": "within normal limits"
    }

    for pattern, replacement in replacements.items():
        text = re.sub(
            pattern, replacement, text, flags=re.IGNORECASE
        )

    return text


# Example
text = "The MRI scan shows a tumor."

processed_text = rephrase_text(text)

print("Original Text :", text)
print("Rephrased Text:", processed_text)

Original Text : The MRI scan shows a tumor.
Rephrased Text: The MRI imaging examination indicates a tumor.


#### 7. Tokenization

In [47]:
# Tokenization
import re

try:                                     # NLTK tokenizer when its data can be downloaded ...
    import nltk
    nltk.download("punkt", quiet=True)
    nltk.download("punkt_tab", quiet=True)
    from nltk.tokenize import word_tokenize
    word_tokenize("test")
    _NLTK_TOKENIZER = True
except Exception:                        # ... otherwise a regex tokenizer (works offline)
    _NLTK_TOKENIZER = False

    def word_tokenize(text):
        return re.findall(r"\w+(?:'\w+)?|[^\w\s]", text)

def tokenize_text(text):
    """Split text into word-level tokens."""
    if not isinstance(text, str):
        return []

    text = re.sub(r"\s+", " ", text).strip()

    if not text:
        return []

    return word_tokenize(text)

# Example
sample_text = "The MRI scan shows a possible brain tumor."

tokens = tokenize_text(sample_text)

print("Tokenizer:", "NLTK" if _NLTK_TOKENIZER else "regex fallback")
print("Original Text:", sample_text)
print("Tokens:", tokens)
print("Number of Tokens:", len(tokens))

Tokenizer: regex fallback
Original Text: The MRI scan shows a possible brain tumor.
Tokens: ['The', 'MRI', 'scan', 'shows', 'a', 'possible', 'brain', 'tumor', '.']
Number of Tokens: 9


In [48]:
# Simple Tokenisation using Python

import re

def simple_tokenize(text):
    """Extract word-like tokens while preserving medical terms."""
    if not isinstance(text, str):
        return []

    return re.findall(r"\b[\w'-]+\b", text.lower())

sample_text = "MRI T1/T2 images show a brain tumor."

tokens = simple_tokenize(sample_text)

print("Tokens:", tokens)
print("Number of Tokens:", len(tokens))

Tokens: ['mri', 't1', 't2', 'images', 'show', 'a', 'brain', 'tumor']
Number of Tokens: 8


#### 8. Text Normalization

In [49]:
# Normalizing Text (i.e., Stemming, Lemmatization etc.)

import re
import unicodedata

def normalize_text(text):
    """
    Normalize textual data by:
    1. Standardizing Unicode characters
    2. Converting text to lowercase
    3. Removing extra whitespace
    4. Standardizing repeated punctuation
    """
    if not isinstance(text, str):
        return ""

    # Standardize Unicode representation
    text = unicodedata.normalize("NFKC", text)

    # Convert to lowercase
    text = text.lower()

    # Replace multiple whitespace characters with a single space
    text = re.sub(r"\s+", " ", text)

    # Standardize repeated punctuation
    text = re.sub(r"([.!?]){2,}", r"\1", text)

    return text.strip()


# Example
sample_text = "  MRI   SCAN shows a BRAIN TUMOR!!!  "

normalized_text = normalize_text(sample_text)

print("Original Text:", repr(sample_text))
print("Normalized Text:", normalized_text)

Original Text: '  MRI   SCAN shows a BRAIN TUMOR!!!  '
Normalized Text: mri scan shows a brain tumor!


In [50]:
# Normalize a text using Pandas Dataframe
import pandas as pd

# Example dataset (made-up report snippets; kept separate from the image DataFrame `df`)
report_df = pd.DataFrame({
    "report_text": [
        " MRI SCAN shows a BRAIN TUMOR!!! ",
        "No   tumor was detected.",
        "PITUITARY gland appears normal."
    ]
})

# Apply normalization
report_df["normalized_text"] = report_df["report_text"].apply(normalize_text)

print(report_df[["report_text", "normalized_text"]])

                         report_text                  normalized_text
0   MRI SCAN shows a BRAIN TUMOR!!!     mri scan shows a brain tumor!
1           No   tumor was detected.           no tumor was detected.
2    PITUITARY gland appears normal.  pituitary gland appears normal.


##### Which text normalization technique have you used and why?

Answer Here.

I used Unicode normalization (NFKC), lowercasing, whitespace normalization, and repeated punctuation normalization to standardize textual data.

Unicode normalization (NFKC): Converts equivalent Unicode representations into a consistent format.

Lowercasing: Converts text to lowercase to reduce inconsistencies caused by capitalization.

Whitespace normalization: Removes leading and trailing spaces and replaces multiple whitespace characters with a single space.

Punctuation normalization: Reduces repeated punctuation, such as !!! to !, to improve consistency.

These techniques help reduce superficial variations in text and make it more consistent for downstream NLP tasks. I preserved medically meaningful terms and negations such as MRI, T1, T2, no, and not to avoid losing clinically relevant information.

#### 9. Part of speech tagging

In [51]:
# POS Taging
import re

try:                                     # NLTK tagger when its data can be downloaded ...
    import nltk
    for _res in ["punkt", "punkt_tab", "averaged_perceptron_tagger", "averaged_perceptron_tagger_eng"]:
        nltk.download(_res, quiet=True)
    nltk.pos_tag(nltk.word_tokenize("test"))
    _NLTK_POS = True
except Exception:                        # ... otherwise a tiny rule-based tagger (works offline)
    _NLTK_POS = False

def _rule_based_pos(tokens):
    determiners = {"the", "a", "an", "this", "that", "these", "those"}
    out = []
    for tok in tokens:
        low = tok.lower()
        if not re.match(r"\w", tok):
            tag = "."
        elif low in determiners:
            tag = "DT"
        elif low in {"is", "are", "was", "were", "be"}:
            tag = "VBZ"
        elif tok.isupper() and len(tok) > 1:
            tag = "NNP"
        elif low.endswith("ing"):
            tag = "VBG"
        elif low.endswith("ed"):
            tag = "VBD"
        elif low.endswith("s") and low[:-1] in {"reveal", "show", "indicate", "appear"}:
            tag = "VBZ"
        elif low.endswith("ly"):
            tag = "RB"
        elif low.endswith(("ible", "able", "al", "ous")):
            tag = "JJ"
        else:
            tag = "NN"
        out.append((tok, tag))
    return out

def perform_pos_tagging(text):
    """Tokenize text and assign part-of-speech tags."""
    if not isinstance(text, str) or not text.strip():
        return []

    if _NLTK_POS:
        return nltk.pos_tag(nltk.word_tokenize(text))
    return _rule_based_pos(re.findall(r"\w+|[^\w\s]", text))


# Example
sample_text = "The MRI scan reveals a possible brain tumor."

pos_tags = perform_pos_tagging(sample_text)

print("Tagger:", "NLTK" if _NLTK_POS else "rule-based fallback")
print("Original Text:", sample_text)
print("\nPOS Tags:")

for word, tag in pos_tags:
    print(f"{word:12} -> {tag}")

Tagger: rule-based fallback
Original Text: The MRI scan reveals a possible brain tumor.

POS Tags:
The          -> DT
MRI          -> NNP
scan         -> NN
reveals      -> VBZ
a            -> DT
possible     -> JJ
brain        -> NN
tumor        -> NN
.            -> .


#### 10. Text Vectorization

In [52]:
# Vectorizing Text
import pandas as pd
from sklearn.feature_extraction.text import TfidfVectorizer

# Uses the made-up `report_df` from the normalization step (NOT the image DataFrame `df`)
report_df["report_text"] = report_df["report_text"].fillna("").astype(str)

tfidf_vectorizer = TfidfVectorizer(
    max_features=1000,
    ngram_range=(1, 2)
)

X_text = tfidf_vectorizer.fit_transform(report_df["report_text"])

print("Vectorized matrix shape:", X_text.shape)

Vectorized matrix shape: (3, 22)


##### Which text vectorization technique have you used and why?

Answer Here.

I used TF-IDF (Term Frequency–Inverse Document Frequency) vectorization to convert textual data into numerical features suitable for machine-learning algorithms.

Why TF-IDF?

Numerical representation: Converts text into a numerical feature matrix.

Word importance: Assigns higher weights to terms that are informative within a document but less common across the document collection.

Reduced influence of common words: Downweights terms that appear frequently across many documents.

Feature control: Parameters such as max_features and ngram_range help control vocabulary size and capture meaningful word combinations.

### 4. Feature Manipulation & Selection

#### 1. Feature Manipulation

In [53]:
# Feature manipulation -> the image preprocessing + augmentation pipeline (applied inside the models)
def build_augmentation(name="augmentation"):
    """Random geometric/contrast transforms, active only during training (random brightness is applied in the tf.data pipeline so the .h5 stays loadable)."""
    return keras.Sequential([
        layers.RandomFlip("horizontal_and_vertical"),
        layers.RandomRotation(0.05, fill_mode="constant"),                       # about +-18 degrees
        layers.RandomZoom(0.10, fill_mode="constant"),
        layers.RandomTranslation(0.05, 0.05, fill_mode="constant"),
        layers.RandomContrast(0.10),
    ], name=name)

# Interactive preview: one MRI, original vs 7 random augmentations
demo = load_rgb(df[df.label == CLASS_NAMES[0]].iloc[0].path, IMG_SIZE).astype("float32")
aug = build_augmentation()
fig = make_subplots(rows=2, cols=4, subplot_titles=["original"] + [f"augmented #{i}" for i in range(1, 8)])
for k in range(8):
    img = demo if k == 0 else aug(demo[None], training=True)[0].numpy()
    fig.add_trace(go.Image(z=np.clip(img, 0, 255).astype("uint8")), row=k // 4 + 1, col=k % 4 + 1)
fig.update_xaxes(visible=False); fig.update_yaxes(visible=False)
fig.update_layout(title="Augmentation preview (rotation, flips, zoom, shift, contrast; brightness jitter is added in the data pipeline)", height=520)
fig.show()

#### 2. Feature Selection

In [54]:
# Select your features wisely to avoid overfitting

# Feature selection -> shortcut audit with interpretable descriptors (group-aware CV, no leakage)
# 1) correlation filter: drop one feature of every pair with |r| > 0.85 (uses the features only, never the labels)
# 2) metadata-only Random Forest scored with Stratified-Group K-Fold CV (groups = source scan, so a scan and its
#    augmented copy never land in different folds). This cell does not depend on the later train/valid/test split.
corr_abs = df[FEATURES].corr().abs()
upper = corr_abs.where(np.triu(np.ones(corr_abs.shape), k=1).astype(bool))
drop = [c for c in upper.columns if (upper[c] > 0.85).any()]
selected = [c for c in FEATURES if c not in drop]
print("Dropped for collinearity:", drop)
print("Selected features:", selected)

X_meta = df[selected].replace([np.inf, -np.inf], np.nan)
y_meta = df["label_id"].values
rf = make_pipeline(SimpleImputer(strategy="median"),
                   RandomForestClassifier(n_estimators=300, random_state=SEED, n_jobs=-1, class_weight="balanced"))
cv_meta = StratifiedGroupKFold(n_splits=5, shuffle=True, random_state=SEED)
pred_meta = cross_val_predict(rf, X_meta, y_meta, cv=cv_meta, groups=df["source_id"])

META_ACC = accuracy_score(y_meta, pred_meta)
META_F1 = f1_score(y_meta, pred_meta, average="macro")
print(f"\nMetadata-only Random Forest (5-fold grouped CV) | accuracy: {META_ACC:.3f} | macro-F1: {META_F1:.3f}")

# Gini importance of the six descriptors (final fit on all images - for interpretation only)
rf.fit(X_meta, y_meta)
imp = pd.Series(rf[-1].feature_importances_, index=selected).sort_values()
fig = px.bar(x=imp.values, y=imp.index, orientation="h", labels={"x": "Gini importance", "y": "Feature"},
             title="MRI metadata-only Random Forest - feature importance")
fig.update_layout(height=400)
fig.show()

Dropped for collinearity: ['entropy']
Selected features: ['brightness', 'contrast', 'fg_ratio', 'sharpness', 'file_kb']

Metadata-only Random Forest (5-fold grouped CV) | accuracy: 0.807 | macro-F1: 0.800


##### What all feature selection methods have you used  and why?

Answer Here.

In my Brain Tumor MRI Classification project, I used correlation-based feature selection and Random Forest feature importance to analyze six interpretable MRI image descriptors. I applied a Pearson correlation threshold of 0.85 to identify and remove redundant features, fitting the filter on the training data to avoid validation leakage. I then used Random Forest Gini importance to rank the remaining features by their contribution to classification. These techniques helped me understand the predictive value of handcrafted image descriptors and establish a metadata-only baseline for comparison with CNN and EfficientNet models. I also recognize that feature importance does not establish medical significance and that patient-level data separation is essential for reliable evaluation.


##### Which all features you found important and why?

Answer Here.

In my Brain Tumor MRI Classification project, I evaluated six handcrafted image features: brightness, contrast, foreground ratio, sharpness, entropy, and file size. I used Random Forest feature importance to determine which features contributed most to classification, while correlation filtering helped reduce redundancy. Brightness and contrast describe intensity characteristics, sharpness captures local intensity changes, entropy measures image complexity, and foreground ratio estimates the non-dark image area. I also examined file size cautiously because it may reflect encoding or dataset artifacts rather than tumor characteristics. I used the resulting feature-importance ranking to understand the metadata-only baseline and compare it with deep-learning models.


### 5. Data Transformation

#### Do you think that your data needs to be transformed? If yes, which transformation have you used. Explain Why?

**Yes.** Pixel intensities (0-255) are rescaled to a range the network trains well on: **[0, 1]** for the custom CNN and **[-1, 1]** for MobileNetV2 / ResNet50V2 (the exact scaling their ImageNet weights were trained with); EfficientNetB0 contains its own normalisation layer. The scaling lives **inside the model**, so the saved `.h5` accepts raw 0-255 images and the Streamlit app cannot apply it wrongly. The skewed sharpness descriptor is log-transformed for visualisation and the baseline.

In [55]:
# Transform Your data

# Data transformation -> intensity normalisation (images) and a log transform for the skewed descriptor
sample_imgs = np.stack([load_rgb(p, 96) for p in df.sample(min(200, len(df)), random_state=SEED).path]).astype("float32")
schemes = {"raw 0-255": sample_imgs, "scaled [0, 1]  (custom CNN)": sample_imgs / 255.0,
           "scaled [-1, 1]  (MobileNetV2, ResNet50V2)": sample_imgs / 127.5 - 1.0}
display(pd.DataFrame({k: dict(min=v.min(), max=v.max(), mean=v.mean(), std=v.std()) for k, v in schemes.items()}).T.round(3))
fig = make_subplots(rows=1, cols=2, subplot_titles=("Sharpness (raw, skewed)", "log10(Sharpness) (near-symmetric)"))
fig.add_trace(go.Histogram(x=df.sharpness, nbinsx=60, marker_color="#4361EE", showlegend=False), 1, 1)
fig.add_trace(go.Histogram(x=np.log10(df.sharpness + 1), nbinsx=60, marker_color="#17BEBB", showlegend=False), 1, 2)
fig.update_layout(height=380, title="Why a log transform helps for skewed descriptors (used for the metadata baseline / plots)")
fig.show()

,min,max,mean,std
raw 0-255,0.0,255.0,43.686001,47.653999
"scaled [0, 1] (custom CNN)",0.0,1.0,0.171000,0.187000
"scaled [-1, 1] (MobileNetV2, ResNet50V2)",-1.0,1.0,-0.657000,0.374000


### 6. Data Scaling

In [56]:
# Scaling your data

# Scaling your data -> in-model Rescaling layers (see build_custom_cnn / build_transfer in Section 7)
SCALING = {"CustomCNN": "Rescaling(1/255)  -> [0, 1]",
           "MobileNetV2": "Rescaling(1/127.5, offset=-1) -> [-1, 1]",
           "ResNet50V2": "Rescaling(1/127.5, offset=-1) -> [-1, 1]",
           "EfficientNetB0": "built-in Rescaling + Normalization (expects raw 0-255)"}
display(pd.Series(SCALING, name="scaling used").to_frame())

,scaling used
CustomCNN,"Rescaling(1/255) -> [0, 1]"
MobileNetV2,"Rescaling(1/127.5, offset=-1) -> [-1, 1]"
ResNet50V2,"Rescaling(1/127.5, offset=-1) -> [-1, 1]"
EfficientNetB0,built-in Rescaling + Normalization (expects ra...


##### Which method have you used to scale you data and why?

**Answer:** *Min-max style fixed scaling* inside the model. A fitted scaler (e.g. StandardScaler) is unnecessary for pixels: the range is known and fixed, there is no train/test statistic to leak, and each pretrained backbone requires the specific scaling it was trained with.

### 7. Dimesionality Reduction

##### Do you think that dimensionality reduction is needed? Explain Why?

Answer Here.

Raw images are very high-dimensional (224x224x3 = 150,528 values), but **the CNN performs its own learned dimensionality reduction** (convolutions -> global average pooling -> 256-2,048 features), so no PCA is applied *before* training. PCA + t-SNE are still used here as a **visual diagnostic** to see whether the classes are separable in raw pixel space.

In [57]:
# DImensionality Reduction (If needed)

# Dimensionality reduction (visual diagnostic): PCA -> t-SNE on 32x32 grayscale thumbnails
# Chart 6.7 - Class separability in raw pixel space

import numpy as np
import pandas as pd
from sklearn.decomposition import PCA
from sklearn.manifold import TSNE
from plotly.subplots import make_subplots
import plotly.graph_objects as go

# 1. Identify the metadata columns
label_candidates = ["label", "class", "tumor_type", "class_name"]
file_candidates = [
    "filename", "file_path", "filepath",
    "image_path", "image", "file", "path"
]

label_col = next(
    (c for c in label_candidates if c in df.columns), None
)
file_col = next(
    (c for c in file_candidates if c in df.columns), None
)

if label_col is None:
    raise ValueError(
        f"No label column found. Available columns: {df.columns.tolist()}"
    )

if file_col is None:
    # Use the DataFrame index as a fallback identifier
    filenames = df.index.astype(str).to_numpy()
else:
    filenames = df[file_col].astype(str).to_numpy()

labels = df[label_col].astype(str).to_numpy()

# 2. Validate aligned image and metadata records
if len(THUMBS) != len(df):
    raise ValueError(
        f"THUMBS contains {len(THUMBS)} images, "
        f"but df contains {len(df)} rows. Align them before sampling."
    )

n = min(CFG["tsne_n"], len(df))

if n < 3:
    raise ValueError("At least 3 images are needed for this t-SNE diagnostic.")

idx = np.random.default_rng(SEED).choice(
    len(df), n, replace=False
)

Xf = THUMBS[idx].reshape(n, -1).astype(np.float32) / 255.0

# 3. PCA dimensionality reduction
n_components = min(50, n - 1, Xf.shape[1])

pca = PCA(
    n_components=n_components,
    random_state=SEED
)

X_pca = pca.fit_transform(Xf)
cum = np.cumsum(pca.explained_variance_ratio_)

# 4. t-SNE visualization
perplexity = min(30, max(1, (n - 1) // 3))

emb = TSNE(
    n_components=2,
    perplexity=perplexity,
    init="pca",
    random_state=SEED,
    learning_rate="auto"
).fit_transform(X_pca)

# 5. Build the visualization DataFrame
tsne_df = pd.DataFrame({
    "tsne1": emb[:, 0],
    "tsne2": emb[:, 1],
    "label": labels[idx],
    "filename": filenames[idx]
})

# 6. Create the two-panel interactive chart
fig = make_subplots(
    rows=1,
    cols=2,
    column_widths=[0.35, 0.65],
    subplot_titles=(
        f"PCA cumulative variance ({n_components} components: "
        f"{cum[-1]:.1%})",
        "t-SNE of MRI thumbnails (hover for image identifier)"
    )
)

fig.add_trace(
    go.Scatter(
        x=np.arange(1, len(cum) + 1),
        y=cum,
        mode="lines+markers",
        name="Cumulative variance",
        showlegend=False
    ),
    row=1, col=1
)

for c in CLASS_NAMES:
    s = tsne_df[tsne_df["label"] == c]

    if s.empty:
        continue

    fig.add_trace(
        go.Scatter(
            x=s["tsne1"],
            y=s["tsne2"],
            mode="markers",
            name=c,
            text=s["filename"],
            customdata=s[["label"]],
            hovertemplate=(
                "Class: %{customdata[0]}<br>"
                "Image: %{text}<br>"
                "t-SNE 1: %{x:.2f}<br>"
                "t-SNE 2: %{y:.2f}<extra></extra>"
            ),
            marker=dict(
                size=5,
                opacity=0.7,
                color=CLASS_COLORS.get(c)
            )
        ),
        row=1, col=2
    )

fig.update_xaxes(title_text="Number of principal components", row=1, col=1)
fig.update_yaxes(title_text="Cumulative explained variance", row=1, col=1)
fig.update_xaxes(title_text="t-SNE 1", row=1, col=2)
fig.update_yaxes(title_text="t-SNE 2", row=1, col=2)

fig.update_layout(
    height=560,
    title="Chart 6.7 — Class Separability in Raw Pixel Space",
    template="plotly_white"
)

fig.show()

##### Which dimensionality reduction technique have you used and why? (If dimensionality reduction done on dataset.)

Answer Here.

**PCA (50 components) followed by t-SNE**, used only for visualisation. t-SNE shows that glioma forms a fairly distinct region while the other classes overlap in raw pixel space - evidence that a *learned* hierarchical representation (CNN / transfer learning) is needed, and that simple linear models on pixels would be insufficient.

### 8. Data Splitting

In [58]:
# Split your data to train and test. Choose Splitting ratio wisely.

# Data splitting -> leakage-safe, stratified, group-aware split (by source scan)
if LEAKAGE_SAFE_RESPLIT:
    # pool every image, then split by SOURCE ID so that a scan and its augmented copy never end up in different splits
    outer = StratifiedGroupKFold(n_splits=6, shuffle=True, random_state=SEED)       # 1/6 -> test
    trval_idx, test_idx = next(outer.split(df, df.label_id, df.source_id))
    inner = StratifiedGroupKFold(n_splits=5, shuffle=True, random_state=SEED)       # 1/5 of the rest -> validation
    tr_rel, va_rel = next(inner.split(df.iloc[trval_idx], df.label_id.iloc[trval_idx], df.source_id.iloc[trval_idx]))
    split = np.empty(len(df), dtype=object)
    split[trval_idx[tr_rel]], split[trval_idx[va_rel]], split[test_idx] = "train", "valid", "test"
    df["split"] = split
else:
    df["split"] = df.original_split

# hard guarantees (the notebook stops if leakage exists)
sets = {s: set(df.loc[df.split == s, "source_id"]) for s in ["train", "valid", "test"]}
assert not (sets["train"] & sets["valid"]) and not (sets["train"] & sets["test"]) and not (sets["valid"] & sets["test"]), "source-scan leakage between splits!"
print("OK - zero source-scan overlap between train / valid / test" if LEAKAGE_SAFE_RESPLIT else "WARNING: using the vendor split (leaky)")

tab = pd.crosstab(df.split, df.label).reindex(["train", "valid", "test"])
tab["total"] = tab.sum(axis=1); tab["% of data"] = (tab.total / tab.total.sum() * 100).round(1)
display(tab)
fig = px.bar(pd.crosstab(df.split, df.label, normalize="index").reindex(["train", "valid", "test"]).mul(100).reset_index()
             .melt(id_vars="split", value_name="percent"), x="split", y="percent", color="label",
             color_discrete_map=CLASS_COLORS, text_auto=".1f", title="Class mix per final split (stratified)")
fig.update_layout(height=400, yaxis_title="% of split"); fig.show()

OK - zero source-scan overlap between train / valid / test


label,glioma,meningioma,no_tumor,pituitary,total,% of data
split,,,,,,
train,537,363,322,407,1629,66.7
valid,134,91,81,101,407,16.7
test,134,91,80,102,407,16.7


#### Load the pixel arrays (resized once, kept as uint8) and build the training inputs

In [59]:
# Load the images once as uint8 arrays at the network resolution
def load_images(frame):
    return np.stack([load_rgb(p, IMG_SIZE) for p in frame.path]).astype(np.uint8)

t0 = time.time()
tr_df, va_df, te_df = (df[df.split == s].reset_index(drop=True) for s in ["train", "valid", "test"])
X_train, y_train = load_images(tr_df), tr_df.label_id.values
X_val,   y_val   = load_images(va_df), va_df.label_id.values
X_test,  y_test  = load_images(te_df), te_df.label_id.values
X_trval = np.concatenate([X_train, X_val]); y_trval = np.concatenate([y_train, y_val])
groups_trval = np.concatenate([tr_df.source_id.values, va_df.source_id.values])
print(f"Loaded in {time.time() - t0:.0f}s | train {X_train.shape} | val {X_val.shape} | test {X_test.shape} | dtype {X_train.dtype}")
print(f"RAM used by image arrays: {(X_train.nbytes + X_val.nbytes + X_test.nbytes + X_trval.nbytes) / 1e6:.0f} MB")

Loaded in 20s | train (1629, 224, 224, 3) | val (407, 224, 224, 3) | test (407, 224, 224, 3) | dtype uint8
RAM used by image arrays: 674 MB


##### What data splitting ratio have you used and why?

Answer Here.

**Stratified, group-aware split of about 67 % train / 17 % validation / 17 % test**, grouped by **source scan ID**.
- *Stratified*: each split keeps the class proportions.
- *Group-aware*: the vendor's own split places augmented copies of the same scan in different folders (27 % of its test images have a sibling in train/valid), which inflates test accuracy; grouping removes this leakage (asserted in code).
- A larger, cleaner test set (~16-17 %) gives less noisy per-class metrics than the vendor's 246 images. The validation set drives early stopping, tuning and model selection; the test set is touched only for the final report.

### 9. Handling Imbalanced Dataset

##### Do you think the dataset is imbalanced? Explain Why.

Answer Here.

**Mildly imbalanced.** Class shares are 32.9 / 25.0 / 22.3 / 19.8 % (glioma / pituitary / meningioma / no tumor), a 1.67:1 ratio. That is not extreme, but it is enough to bias an unweighted model toward glioma and to make plain accuracy a flattering metric.

In [60]:
# Handling Imbalanced Dataset (If needed)

# Handling the imbalanced dataset -> inverse-frequency class weights (no synthetic MRI data)
def compute_cw(y):
    w = compute_class_weight("balanced", classes=np.arange(N_CLASSES), y=y)
    return {i: float(v) for i, v in enumerate(w)}

CLASS_WEIGHT = compute_cw(y_train)
cw_df = pd.DataFrame({"class": CLASS_NAMES, "train_images": np.bincount(y_train, minlength=N_CLASSES),
                      "class_weight": [CLASS_WEIGHT[i] for i in range(N_CLASSES)]})
display(cw_df.round(3))
fig = make_subplots(rows=1, cols=2, subplot_titles=("Training images per class", "Class weight used in the loss"))
fig.add_trace(go.Bar(x=cw_df["class"], y=cw_df.train_images, marker_color=[CLASS_COLORS[c] for c in cw_df["class"]], showlegend=False), 1, 1)
fig.add_trace(go.Bar(x=cw_df["class"], y=cw_df.class_weight, marker_color=[CLASS_COLORS[c] for c in cw_df["class"]], showlegend=False,
                     text=cw_df.class_weight.round(2), textposition="outside"), 1, 2)
fig.update_layout(height=380); fig.show()

,class,train_images,class_weight
0,glioma,537,0.758
1,meningioma,363,1.122
2,no_tumor,322,1.265
3,pituitary,407,1.001


##### What technique did you use to handle the imbalance dataset and why? (If needed to be balanced)

Answer Here.

**Class weights** (`class_weight='balanced'`): the loss of a mistake on a minority class is multiplied by n_samples / (n_classes x n_class_samples), so rarer classes count more. Oversampling or GAN/SMOTE-style synthetic images were rejected because (a) the imbalance is mild, (b) duplicating scans would add more near-duplicates and weaken validation, and (c) synthetic MRI pixels are hard to justify clinically. Macro-averaged metrics are used for model selection so that the smaller classes carry equal weight.

## ***7. ML Model Implementation***

### 7.0 Shared utilities (data pipeline, model builders, training, evaluation dashboards, Grad-CAM)
Everything below is written once so each model section stays short and every model is trained and judged under **identical conditions**.

In [61]:
# ── 7.0 Shared utilities ─────────────────────────────────────────────────────
from tensorflow.keras.callbacks import EarlyStopping, ModelCheckpoint, ReduceLROnPlateau

AUTOTUNE = tf.data.AUTOTUNE
RESULTS, MODELS, BASE_LAYER, TUNING = {}, {}, {}, {}
FT_LR = 1e-5                                    # learning rate for backbone fine-tuning
UNFREEZE = {"MobileNetV2": 30, "EfficientNetB0": 30, "ResNet50V2": 40}   # top layers unfrozen in phase 2

def make_ds(X, y=None, training=False):
    """tf.data pipeline: uint8 arrays -> float32 0-255 batches (scaling happens inside the model)."""
    ds = tf.data.Dataset.from_tensor_slices(X if y is None else (X, y))
    if training:
        ds = ds.shuffle(min(len(X), 4096), seed=SEED, reshuffle_each_iteration=True)
    ds = ds.batch(BATCH_SIZE)
    def prep(a):
        a = tf.cast(a, tf.float32)
        if training:                                   # brightness jitter (+-10 % of range), kept out of the model for .h5 compatibility
            a = tf.clip_by_value(tf.image.random_brightness(a, 25.5), 0.0, 255.0)
        return a
    fn = prep if y is None else (lambda a, b: (prep(a), b))
    return ds.map(fn, num_parallel_calls=AUTOTUNE).prefetch(AUTOTUNE)

ds_train, ds_val, ds_test = make_ds(X_train, y_train, True), make_ds(X_val, y_val), make_ds(X_test, y_test)

def compile_model(model, lr):
    model.compile(optimizer=keras.optimizers.Adam(lr), loss="sparse_categorical_crossentropy", metrics=["accuracy"])
    return model

# ---------- model 1: custom CNN ----------
def build_custom_cnn(base_filters=32, convs=(1, 1, 2, 2), dropout=0.4, dense=128, lr=1e-3, l2=1e-4):
    reg = keras.regularizers.l2(l2)
    inp = keras.Input((IMG_SIZE, IMG_SIZE, 3), name="mri")
    x = build_augmentation()(inp)                                   # active only while training
    x = layers.Rescaling(1.0 / 255)(x)                              # pixels -> [0, 1]
    for i, n_conv in enumerate(convs):                              # 4 conv stages: 32-64-128-256 filters
        for j in range(n_conv):
            x = layers.Conv2D(base_filters * 2 ** i, 3, padding="same", use_bias=False, kernel_regularizer=reg)(x)
            x = layers.BatchNormalization()(x)
            last = (i == len(convs) - 1 and j == n_conv - 1)
            x = layers.Activation("relu", name="last_conv" if last else None)(x)    # Grad-CAM target layer
        x = layers.MaxPooling2D()(x)
    x = layers.GlobalAveragePooling2D()(x)
    x = layers.Dropout(dropout)(x)
    x = layers.Dense(dense, activation="relu", kernel_regularizer=reg)(x)
    x = layers.BatchNormalization()(x)
    x = layers.Dropout(dropout)(x)
    out = layers.Dense(N_CLASSES, activation="softmax")(x)
    return compile_model(keras.Model(inp, out, name="CustomCNN"), lr)

# ---------- models 2-4: transfer learning ----------
TRANSFER_SPECS = {
    "MobileNetV2":    dict(ctor=keras.applications.MobileNetV2,    prep="tf"),     # expects [-1, 1]
    "EfficientNetB0": dict(ctor=keras.applications.EfficientNetB0, prep="none"),   # has its own rescaling (raw 0-255)
    "ResNet50V2":     dict(ctor=keras.applications.ResNet50V2,     prep="tf"),     # expects [-1, 1]
}

def build_transfer(key, units=256, dropout=0.3, lr=1e-3, l2=1e-4):
    spec = TRANSFER_SPECS[key]
    inp = keras.Input((IMG_SIZE, IMG_SIZE, 3), name="mri")
    x = build_augmentation()(inp)
    if spec["prep"] == "tf":
        x = layers.Rescaling(1.0 / 127.5, offset=-1.0)(x)
    base = spec["ctor"](include_top=False, weights=WEIGHTS, input_shape=(IMG_SIZE, IMG_SIZE, 3))
    base.trainable = False                                           # phase 1: frozen feature extractor
    BASE_LAYER[key] = base.name
    x = base(x, training=False)                                      # keep BatchNorm in inference mode
    x = layers.GlobalAveragePooling2D()(x)
    x = layers.Dropout(dropout)(x)
    x = layers.Dense(units, activation="relu", kernel_regularizer=keras.regularizers.l2(l2))(x)
    x = layers.Dropout(dropout)(x)
    out = layers.Dense(N_CLASSES, activation="softmax")(x)
    return compile_model(keras.Model(inp, out, name=key), lr)

def unfreeze_top(model, key):
    """Phase 2: unfreeze the top N backbone layers (BatchNorm stays frozen) and recompile with a tiny LR."""
    base = model.get_layer(BASE_LAYER[key]); base.trainable = True
    n = UNFREEZE[key]
    for l in base.layers[:-n]:
        l.trainable = False
    for l in base.layers[-n:]:
        l.trainable = not isinstance(l, layers.BatchNormalization)
    compile_model(model, FT_LR)
    print(f"Fine-tuning: {sum(l.trainable for l in base.layers)} of {len(base.layers)} backbone layers are trainable.")

# ---------- training ----------
def train_model(model, name, ep, tag="", patience=6, cw=None, ds_tr=None, ds_va=None):
    cbs = [EarlyStopping(monitor="val_loss", patience=patience, restore_best_weights=True, verbose=1),
           ModelCheckpoint(str(MODELS_DIR / f"{name}{tag}.weights.h5"), monitor="val_loss", save_best_only=True, save_weights_only=True),
           ReduceLROnPlateau(monitor="val_loss", factor=0.5, patience=max(2, patience // 2), min_lr=1e-7, verbose=1)]
    t0 = time.time()
    h = model.fit(ds_train if ds_tr is None else ds_tr, validation_data=ds_val if ds_va is None else ds_va, epochs=ep,
                  class_weight=CLASS_WEIGHT if cw is None else cw, callbacks=cbs, verbose=2)
    return h.history, time.time() - t0

def merge_hist(h1, h2):
    return {k: list(h1[k]) + list(h2.get(k, [])) for k in h1}

# ---------- evaluation ----------
def evaluate_model(model, name, stage, history=None, seconds=None, ft_start=None):
    t0 = time.time(); proba = model.predict(make_ds(X_test), verbose=0)
    infer_ms = (time.time() - t0) / len(X_test) * 1000
    pred = proba.argmax(1); vpred = model.predict(make_ds(X_val), verbose=0).argmax(1)
    p, r, f1, _ = precision_recall_fscore_support(y_test, pred, average="macro", zero_division=0)
    try:
        auc = roc_auc_score(y_test, proba, multi_class="ovr", average="macro")
    except ValueError:
        auc = float("nan")
    m = dict(model=name, stage=stage, accuracy=accuracy_score(y_test, pred), precision=p, recall=r, f1_macro=f1, roc_auc=auc,
             val_accuracy=accuracy_score(y_val, vpred), val_f1_macro=f1_score(y_val, vpred, average="macro"),
             params_M=model.count_params() / 1e6, infer_ms=infer_ms, train_min=(seconds or 0) / 60)
    RESULTS[(name, stage)] = dict(metrics=m, y_pred=pred, proba=proba, ft_start=ft_start,
                                  history={k: [float(v) for v in vals] for k, vals in (history or {}).items()})
    MODELS[(name, stage)] = model
    print(f"[{name} | {stage}] test acc {m['accuracy']:.3f} | macro-P {p:.3f} | macro-R {r:.3f} | macro-F1 {f1:.3f} | AUC {auc:.3f} | val macro-F1 {m['val_f1_macro']:.3f}")
    return m

def metrics_table():
    return pd.DataFrame([v["metrics"] for v in RESULTS.values()]).round(4)

# ---------- interactive dashboards ----------
def plot_history(name, stage):
    r = RESULTS[(name, stage)]; h = r["history"]; ep = list(range(1, len(h["loss"]) + 1))
    fig = make_subplots(rows=1, cols=2, subplot_titles=("Loss (lower is better)", "Accuracy (higher is better)"))
    for key, dash, col in [("loss", "solid", 1), ("val_loss", "dash", 1), ("accuracy", "solid", 2), ("val_accuracy", "dash", 2)]:
        fig.add_trace(go.Scatter(x=ep, y=h[key], mode="lines+markers", name=key.replace("_", " "),
                                 line=dict(dash=dash, color="#4361EE" if "val" not in key else "#E4572E")), 1, col)
    if r["ft_start"]:
        for col in (1, 2):
            fig.add_vline(x=r["ft_start"] + 0.5, line_dash="dot", line_color="grey", row=1, col=col)
        fig.add_annotation(x=r["ft_start"] + 0.5, y=1, yref="paper", text="fine-tuning starts", showarrow=False, xanchor="left")
    fig.update_layout(title=f"Training history - {name} ({stage})", height=400, xaxis_title="epoch", xaxis2_title="epoch")
    fig.show()

def plot_eval(name, stage):
    r = RESULTS[(name, stage)]; pred, proba = r["y_pred"], r["proba"]
    cm = confusion_matrix(y_test, pred, labels=range(N_CLASSES)); cmn = cm / cm.sum(1, keepdims=True) * 100
    p, rc, f1, _ = precision_recall_fscore_support(y_test, pred, labels=range(N_CLASSES), zero_division=0)
    fig = make_subplots(rows=1, cols=3, column_widths=[0.34, 0.33, 0.33],
                        subplot_titles=("Confusion matrix (row %, counts in cells)", "Per-class precision / recall / F1", "ROC curves (one-vs-rest)"))
    fig.add_trace(go.Heatmap(z=cmn, x=CLASS_NAMES, y=CLASS_NAMES, text=cm, texttemplate="%{text}", colorscale="Blues",
                             zmin=0, zmax=100, showscale=False), 1, 1)
    fig.update_yaxes(autorange="reversed", row=1, col=1)
    for nm, vals, colr in [("Precision", p, "#4361EE"), ("Recall", rc, "#E4572E"), ("F1", f1, "#76B041")]:
        fig.add_trace(go.Bar(x=CLASS_NAMES, y=vals, name=nm, marker_color=colr), 1, 2)
    for i, c in enumerate(CLASS_NAMES):
        if (y_test == i).any():
            fpr, tpr, _ = roc_curve((y_test == i).astype(int), proba[:, i])
            fig.add_trace(go.Scatter(x=fpr, y=tpr, mode="lines", name=f"{c} AUC {roc_auc_score((y_test == i).astype(int), proba[:, i]):.3f}",
                                     line=dict(color=CLASS_COLORS[c])), 1, 3)
    fig.add_trace(go.Scatter(x=[0, 1], y=[0, 1], mode="lines", line=dict(dash="dot", color="grey"), showlegend=False), 1, 3)
    fig.update_layout(title=f"Test-set evaluation - {name} ({stage}) | accuracy {r['metrics']['accuracy']:.3f}, macro-F1 {r['metrics']['f1_macro']:.3f}",
                      height=460, barmode="group", legend=dict(orientation="h", y=-0.2))
    fig.update_yaxes(range=[0, 1.05], row=1, col=2)
    fig.show()
    print(classification_report(y_test, pred, target_names=CLASS_NAMES, digits=3, zero_division=0))

def show_improvement(name):
    b, t = RESULTS[(name, "baseline")]["metrics"], RESULTS[(name, "tuned")]["metrics"]
    keys = ["accuracy", "precision", "recall", "f1_macro", "roc_auc"]
    fig = go.Figure([go.Bar(name="baseline", x=keys, y=[b[k] for k in keys], marker_color="#9AA5B1", text=[f"{b[k]:.3f}" for k in keys], textposition="outside"),
                     go.Bar(name="tuned", x=keys, y=[t[k] for k in keys], marker_color="#4361EE", text=[f"{t[k]:.3f}" for k in keys], textposition="outside")])
    lo = max(0.0, min(min(b[k], t[k]) for k in keys if not np.isnan(b[k]) and not np.isnan(t[k])) - 0.08)
    fig.update_layout(barmode="group", title=f"{name}: baseline vs tuned (test set)", yaxis=dict(range=[lo, 1.04]), height=430)
    fig.show()
    delta = pd.DataFrame({"baseline": [b[k] for k in keys], "tuned": [t[k] for k in keys]}, index=keys)
    delta["change (pp)"] = (delta.tuned - delta.baseline) * 100
    display(delta.round(4))

# ---------- transfer-learning tuning: cached embeddings + grouped CV random search, then 2-phase fine-tuning ----------
FOLDS = list(StratifiedGroupKFold(n_splits=CFG["cv_folds"], shuffle=True, random_state=SEED).split(X_trval, y_trval, groups_trval))

def extract_embeddings(key, X):
    spec = TRANSFER_SPECS[key]; inp = keras.Input((IMG_SIZE, IMG_SIZE, 3)); x = inp
    if spec["prep"] == "tf":
        x = layers.Rescaling(1.0 / 127.5, offset=-1.0)(x)
    base = spec["ctor"](include_top=False, weights=WEIGHTS, input_shape=(IMG_SIZE, IMG_SIZE, 3))
    return keras.Model(inp, layers.GlobalAveragePooling2D()(base(x, training=False))).predict(make_ds(X), verbose=0)

def build_head(dim, units, dropout, lr, l2):
    return compile_model(keras.Sequential([keras.Input((dim,)), layers.Dropout(dropout),
        layers.Dense(units, activation="relu", kernel_regularizer=keras.regularizers.l2(l2)), layers.Dropout(dropout),
        layers.Dense(N_CLASSES, activation="softmax")]), lr)

def tune_transfer(key):
    t0 = time.time(); rng = np.random.default_rng(SEED)
    feats = extract_embeddings(key, X_trval)                                   # backbone is frozen -> embed once
    print(f"{key}: cached embeddings {feats.shape} in {time.time() - t0:.0f}s")
    rows_ = []
    for t in range(CFG["trials"] * 2):                                         # heads are cheap -> twice as many trials
        cfg = dict(units=int(rng.choice([128, 256, 512])), dropout=float(rng.choice([0.2, 0.3, 0.5])),
                   lr=float(10 ** rng.uniform(-3.5, -2.5)), l2=float(rng.choice([1e-5, 1e-4, 1e-3])))
        scores = []
        for tr, va in FOLDS:
            head = build_head(feats.shape[1], **cfg)
            head.fit(feats[tr], y_trval[tr], epochs=CFG["head_ep"], batch_size=BATCH_SIZE, class_weight=compute_cw(y_trval[tr]), verbose=0)
            scores.append(f1_score(y_trval[va], head.predict(feats[va], verbose=0).argmax(1), average="macro"))
        rows_.append({**cfg, "cv_macro_f1": float(np.mean(scores)), "cv_std": float(np.std(scores))})
    res = pd.DataFrame(rows_).sort_values("cv_macro_f1", ascending=False).reset_index(drop=True)
    best = {k: (int(res.loc[0, k]) if k == "units" else float(res.loc[0, k])) for k in ["units", "dropout", "lr", "l2"]}
    plot_df = res.assign(log10_lr=np.log10(res.lr), log10_l2=np.log10(res.l2))
    px.parallel_coordinates(plot_df, dimensions=["units", "dropout", "log10_lr", "log10_l2", "cv_macro_f1"], color="cv_macro_f1",
                            color_continuous_scale="Viridis", title=f"{key}: random-search trials ({CFG['cv_folds']}-fold grouped CV macro-F1)").update_layout(height=420).show()
    display(res.head(5).round(4))
    print(f"Best head: {best} | CV macro-F1 {res.loc[0, 'cv_macro_f1']:.3f} +- {res.loc[0, 'cv_std']:.3f}")

    keras.utils.set_random_seed(SEED)
    model = build_transfer(key, **best)                                        # phase 1: train the tuned head
    h1, s1 = train_model(model, key, CFG["ep_head"], tag="_tuned_head")
    unfreeze_top(model, key)                                                   # phase 2: fine-tune top backbone layers
    h2, s2 = train_model(model, key, CFG["ep_ft"], tag="_tuned_ft", patience=5)
    hist = merge_hist(h1, h2)
    TUNING[key] = dict(table=res, best=best)
    evaluate_model(model, key, "tuned", hist, time.time() - t0, ft_start=len(h1["loss"]))   # wall time incl. search + CV
    return model

def run_transfer_baseline(key):
    keras.utils.set_random_seed(SEED)
    model = build_transfer(key)
    print(f"{key}: {model.count_params() / 1e6:.2f}M parameters, backbone frozen")
    hist, secs = train_model(model, key, CFG["ep_head"] + 4, tag="_baseline")
    evaluate_model(model, key, "baseline", hist, secs)
    return model

# ---------- Grad-CAM ----------
def make_gradcam(model, img, layer_name, class_index=None):
    layer = model.get_layer(layer_name)
    gm = keras.Model(model.inputs, [layer.output, model.output])
    with tf.GradientTape() as tape:
        conv, preds = gm(tf.convert_to_tensor(img[None].astype("float32")), training=False)
        idx = int(tf.argmax(preds[0])) if class_index is None else int(class_index)
        score = preds[:, idx]
    grads = tape.gradient(score, conv)
    w = tf.reduce_mean(grads, axis=(1, 2), keepdims=True)
    cam = tf.nn.relu(tf.reduce_sum(w * conv, axis=-1))[0].numpy()
    return cam / (cam.max() + 1e-8), idx, preds[0].numpy()

def overlay_cam(img, cam, alpha=0.45):
    cam_r = np.asarray(Image.fromarray((cam * 255).astype(np.uint8)).resize(img.shape[1::-1], Image.BILINEAR)) / 255.0
    heat = (plt.get_cmap("jet")(cam_r)[..., :3] * 255).astype(np.uint8)
    return ((1 - alpha) * img + alpha * heat).astype(np.uint8)

def gradcam_layer(name):
    return "last_conv" if name == "CustomCNN" else BASE_LAYER[name]

print("Utilities ready. Train / val / test batches:", len(ds_train), len(ds_val), len(ds_test))

Utilities ready. Train / val / test batches: 51 13 13


### ML Model - 1

In [62]:
# ML Model - 1 Implementation : Custom CNN built from scratch (baseline configuration)

keras.utils.set_random_seed(SEED)
cnn_base = build_custom_cnn()
cnn_base.summary(line_length=100)

# Fit the Algorithm (EarlyStopping + ModelCheckpoint + ReduceLROnPlateau, class-weighted loss)

hist, secs = train_model(cnn_base, "CustomCNN", CFG["ep_base"], tag="_baseline")

# Predict on the model test set and store all metrics
evaluate_model(cnn_base, "CustomCNN", "baseline", hist, secs)

Model: "CustomCNN"

┏━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━┳━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━┳━━━━━━━━━━━━━━━━━━━┓
┃ Layer (type)                               ┃ Output Shape                    ┃           Param # ┃
┡━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━╇━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━╇━━━━━━━━━━━━━━━━━━━┩
│ mri (InputLayer)                           │ (None, 224, 224, 3)             │                 0 │
├────────────────────────────────────────────┼─────────────────────────────────┼───────────────────┤
│ augmentation (Sequential)                  │ (None, 224, 224, 3)             │                 0 │
├────────────────────────────────────────────┼─────────────────────────────────┼───────────────────┤
│ rescaling (Rescaling)                      │ (None, 224, 224, 3)             │                 0 │
├────────────────────────────────────────────┼─────────────────────────────────┼───────────────────┤
│ conv2d (Conv2D)                            │ (None, 224, 224, 32)            │               864 │
├────────────────────────────────────────────┼─────────────────────────────────┼───────────────────┤
│ batch_normalization (BatchNormalization)   │ (None, 224, 224, 32)            │               128 │
├────────────────────────────────────────────┼─────────────────────────────────┼───────────────────┤
│ activation (Activation)                    │ (None, 224, 224, 32)            │                 0 │
├────────────────────────────────────────────┼─────────────────────────────────┼───────────────────┤
│ max_pooling2d (MaxPooling2D)               │ (None, 112, 112, 32)            │                 0 │
├────────────────────────────────────────────┼─────────────────────────────────┼───────────────────┤
│ conv2d_1 (Conv2D)                          │ (None, 112, 112, 64)            │            18,432 │
├────────────────────────────────────────────┼─────────────────────────────────┼───────────────────┤
│ batch_normalization_1 (BatchNormalization) │ (None, 112, 112, 64)            │               256 │
├────────────────────────────────────────────┼─────────────────────────────────┼───────────────────┤
│ activation_1 (Activation)                  │ (None, 112, 112, 64)            │                 0 │
├────────────────────────────────────────────┼─────────────────────────────────┼───────────────────┤
│ max_pooling2d_1 (MaxPooling2D)             │ (None, 56, 56, 64)              │                 0 │
├────────────────────────────────────────────┼─────────────────────────────────┼───────────────────┤
│ conv2d_2 (Conv2D)                          │ (None, 56, 56, 128)             │            73,728 │
├────────────────────────────────────────────┼─────────────────────────────────┼───────────────────┤
│ batch_normalization_2 (BatchNormalization) │ (None, 56, 56, 128)             │               512 │
├────────────────────────────────────────────┼─────────────────────────────────┼───────────────────┤
│ activation_2 (Activation)                  │ (None, 56, 56, 128)             │                 0 │
├────────────────────────────────────────────┼─────────────────────────────────┼───────────────────┤
│ conv2d_3 (Conv2D)                          │ (None, 56, 56, 128)             │           147,456 │
├────────────────────────────────────────────┼─────────────────────────────────┼───────────────────┤
│ batch_normalization_3 (BatchNormalization) │ (None, 56, 56, 128)             │               512 │
├────────────────────────────────────────────┼─────────────────────────────────┼───────────────────┤
│ activation_3 (Activation)                  │ (None, 56, 56, 128)             │                 0 │
├────────────────────────────────────────────┼─────────────────────────────────┼───────────────────┤
│ max_pooling2d_2 (MaxPooling2D)             │ (None, 28, 28, 128)             │                 0 │
├────────────────────────────────────────────┼─────────────────────────────────┼───────────────────┤
│ conv2d_4 (Conv2D)                          │ (None, 28, 28,

 Total params: 1,162,596 (4.43 MB)

 Trainable params: 1,160,612 (4.43 MB)

 Non-trainable params: 1,984 (7.75 KB)

Epoch 1/30
51/51 - 392s - 8s/step - accuracy: 0.5684 - loss: 1.3783 - val_accuracy: 0.3759 - val_loss: 1.4855 - learning_rate: 0.0010
Epoch 2/30
51/51 - 367s - 7s/step - accuracy: 0.6636 - loss: 1.0775 - val_accuracy: 0.3292 - val_loss: 3.2012 - learning_rate: 0.0010
Epoch 3/30
51/51 - 383s - 8s/step - accuracy: 0.6888 - loss: 0.9690 - val_accuracy: 0.3292 - val_loss: 3.2118 - learning_rate: 0.0010
Epoch 4/30

Epoch 4: ReduceLROnPlateau reducing learning rate to 0.0005000000237487257.
51/51 - 417s - 8s/step - accuracy: 0.6961 - loss: 0.9702 - val_accuracy: 0.3292 - val_loss: 5.0691 - learning_rate: 0.0010
Epoch 5/30
51/51 - 342s - 7s/step - accuracy: 0.7219 - loss: 0.8744 - val_accuracy: 0.3292 - val_loss: 5.5796 - learning_rate: 5.0000e-04
Epoch 6/30
51/51 - 353s - 7s/step - accuracy: 0.7244 - loss: 0.8054 - val_accuracy: 0.3292 - val_loss: 4.9439 - learning_rate: 5.0000e-04
Epoch 7/30

Epoch 7: ReduceLROnPlateau reducing learning rate to 0.0002500000118743628.
51/51 - 416s - 8s/step 

{'model': 'CustomCNN',
 'stage': 'baseline',
 'accuracy': 0.3783783783783784,
 'precision': 0.22113226008513442,
 'recall': 0.299612152553329,
 'f1_macro': 0.2079550734722025,
 'roc_auc': 0.7838890695966616,
 'val_accuracy': 0.3759213759213759,
 'val_f1_macro': 0.20671171653374726,
 'params_M': 1.162596,
 'infer_ms': 46.62677872678864,
 'train_min': 44.49718399047852}

#### 1. Explain the ML Model used and it's performance using Evaluation metric Score Chart.

**Custom CNN (from scratch).** Input 224x224x3 -> in-model augmentation (training only) -> `Rescaling(1/255)` -> **four convolutional stages** (32-64-128-256 filters; 1-1-2-2 `Conv3x3 -> BatchNorm -> ReLU` blocks, each stage closed by `MaxPooling`) -> **Global Average Pooling** (far fewer parameters than Flatten, less over-fitting, and it gives spatially meaningful maps for Grad-CAM) -> `Dropout` -> `Dense(128)` -> `BatchNorm` -> `Dropout` -> `Dense(4, softmax)`. Loss: class-weighted sparse categorical cross-entropy; optimiser Adam (lr 1e-3, halved on plateau); early stopping on validation loss.

The dashboard below shows training curves, the confusion matrix, per-class precision / recall / F1 and one-vs-rest ROC curves on the **leakage-free test set**.

In [63]:
# Visualizing evaluation Metric Score chart

# Visualizing evaluation Metric Score chart - Custom CNN (baseline)
plot_history("CustomCNN", "baseline")
plot_eval("CustomCNN", "baseline")

              precision    recall  f1-score   support

      glioma      0.398     1.000     0.569       134
  meningioma      0.182     0.022     0.039        91
    no_tumor      0.000     0.000     0.000        80
   pituitary      0.305     0.176     0.224       102

    accuracy                          0.378       407
   macro avg      0.221     0.300     0.208       407
weighted avg      0.248     0.378     0.252       407



#### 2. Cross- Validation & Hyperparameter Tuning

In [64]:

# Memory management utilities for TensorFlow/Keras
import gc
import tensorflow as tf
from tensorflow import keras

def free_memory():
    """Release unused Python objects and clear the Keras session."""
    try:
        keras.backend.clear_session()
    except Exception:
        pass

    gc.collect()

    # Clear GPU memory if a supported GPU is available.
    # Safe to skip when running on CPU.
    try:
        for gpu in tf.config.list_logical_devices("GPU"):
            tf.config.experimental.reset_memory_stats(gpu.name)
    except (RuntimeError, ValueError, AttributeError):
        pass

print("Memory management function defined successfully.")
print("TensorFlow GPU devices:", tf.config.list_physical_devices("GPU"))


Memory management function defined successfully.
TensorFlow GPU devices: []


In [65]:
# ML Model - 1 Implementation with hyperparameter optimization techniques (i.e., GridSearch CV, RandomSearch CV, Bayesian Optimization etc.)

# Fit the Algorithm

# Predict on the model

# ML Model - 1 with hyper-parameter optimisation: Random Search + Stratified-Group K-Fold cross-validation
# Memory-safe: every trial / fold releases its model (free_memory) and an out-of-memory trial is skipped instead of crashing the run.

rng = np.random.default_rng(SEED)
t0 = time.time()
trials = []

DEFAULT_CFG = dict(
    base_filters=32,
    dense=128,
    dropout=0.4,
    lr=1e-3,
    l2=1e-4
)

for t in range(CFG["trials"]):
    cfg = dict(
        base_filters=int(rng.choice([24, 32, 48])),
        dropout=float(rng.choice([0.3, 0.4, 0.5])),
        dense=int(rng.choice([64, 128, 256])),
        lr=float(10 ** rng.uniform(-3.5, -2.5)),
        l2=float(rng.choice([1e-5, 1e-4, 1e-3]))
    )

    free_memory()
    f1 = float("nan")
    m = None

    try:
        m = build_custom_cnn(**cfg)

        m.fit(
            ds_train,
            validation_data=ds_val,
            epochs=CFG["ep_search"],
            class_weight=CLASS_WEIGHT,
            verbose=0
        )

        predictions = m.predict(
            make_ds(X_val),
            verbose=0
        ).argmax(axis=1)

        f1 = f1_score(
            y_val,
            predictions,
            average="macro"
        )

        print(
            f"Trial {t + 1}/{CFG['trials']}: "
            f"macro-F1 = {f1:.4f}"
        )

    except OOM_ERRORS as e:
        print(
            f"Trial {t + 1}/{CFG['trials']} skipped: "
            f"{type(e).__name__}"
        )

    finally:
        if m is not None:
            del m
        free_memory()

    trials.append({**cfg, "val_macro_f1": f1})

trials_df = (
    pd.DataFrame(trials)
    .dropna(subset=["val_macro_f1"])
    .sort_values("val_macro_f1", ascending=False)
    .reset_index(drop=True)
)

if trials_df.empty:
    print("No search trial completed. Using baseline configuration.")
    best_cfg = DEFAULT_CFG.copy()
else:
    best_cfg = {
        "base_filters": int(trials_df.iloc[0]["base_filters"]),
        "dense": int(trials_df.iloc[0]["dense"]),
        "dropout": float(trials_df.iloc[0]["dropout"]),
        "lr": float(trials_df.iloc[0]["lr"]),
        "l2": float(trials_df.iloc[0]["l2"])
    }

    display(trials_df.round(4))

print("Best configuration:", best_cfg)

cv_scores = []                                                   # 2) grouped K-fold CV of the best configuration
for k, (tr, va) in enumerate(FOLDS, 1):
    free_memory()
    try:
        m = build_custom_cnn(**best_cfg)
        m.fit(make_ds(X_trval[tr], y_trval[tr], True), validation_data=make_ds(X_trval[va], y_trval[va]), epochs=CFG["ep_cv"],
              class_weight=compute_cw(y_trval[tr]), verbose=0)
        s = f1_score(y_trval[va], m.predict(make_ds(X_trval[va]), verbose=0).argmax(1), average="macro")
        cv_scores.append(s); print(f"fold {k}/{len(FOLDS)}: macro-F1 {s:.3f}"); del m
    except OOM_ERRORS as e:
        print(f"fold {k}/{len(FOLDS)}: SKIPPED, out of memory ({type(e).__name__})")
    free_memory()
if cv_scores:
    fig = px.bar(x=[f"fold {i + 1}" for i in range(len(cv_scores))], y=cv_scores, text=[f"{s:.3f}" for s in cv_scores],
                 title=f"Custom CNN - {len(cv_scores)}-fold grouped CV macro-F1: {np.mean(cv_scores):.3f} +- {np.std(cv_scores):.3f}")
    fig.update_layout(height=360, yaxis_title="macro-F1", xaxis_title=""); fig.show()
TUNING["CustomCNN"] = dict(table=trials_df, best=best_cfg, cv=cv_scores)

free_memory()                                                    # 3) retrain the best configuration with the full schedule
keras.utils.set_random_seed(SEED)
cnn_tuned = build_custom_cnn(**best_cfg)
hist, secs = train_model(cnn_tuned, "CustomCNN", CFG["ep_base"], tag="_tuned")
evaluate_model(cnn_tuned, "CustomCNN", "tuned", hist, time.time() - t0)   # wall time incl. search + CV
plot_history("CustomCNN", "tuned"); plot_eval("CustomCNN", "tuned")


Trial 1/4: macro-F1 = 0.1360
Trial 2/4: macro-F1 = 0.3535
Trial 3/4: macro-F1 = 0.1425
Trial 4/4: macro-F1 = 0.1661


,base_filters,dropout,dense,lr,l2,val_macro_f1
0,24,0.5,64,0.0030,0.0000,0.3535
1,48,0.4,128,0.0027,0.0001,0.1661
2,48,0.5,256,0.0004,0.0010,0.1425
3,24,0.5,128,0.0023,0.0001,0.1360


Best configuration: {'base_filters': 24, 'dense': 64, 'dropout': 0.5, 'lr': 0.0029896637915229844, 'l2': 1e-05}
fold 1/3: macro-F1 0.352
fold 2/3: macro-F1 0.671
fold 3/3: macro-F1 0.313


Epoch 1/30
51/51 - 230s - 5s/step - accuracy: 0.5316 - loss: 1.3925 - val_accuracy: 0.4226 - val_loss: 1.8205 - learning_rate: 0.0030
Epoch 2/30
51/51 - 223s - 4s/step - accuracy: 0.5887 - loss: 1.1390 - val_accuracy: 0.3342 - val_loss: 1.6656 - learning_rate: 0.0030
Epoch 3/30
51/51 - 227s - 4s/step - accuracy: 0.6470 - loss: 1.0188 - val_accuracy: 0.3366 - val_loss: 1.8356 - learning_rate: 0.0030
Epoch 4/30
51/51 - 223s - 4s/step - accuracy: 0.6501 - loss: 0.9166 - val_accuracy: 0.4324 - val_loss: 2.1159 - learning_rate: 0.0030
Epoch 5/30

Epoch 5: ReduceLROnPlateau reducing learning rate to 0.001494831871241331.
51/51 - 229s - 4s/step - accuracy: 0.6826 - loss: 0.8598 - val_accuracy: 0.4054 - val_loss: 2.4538 - learning_rate: 0.0030
Epoch 6/30
51/51 - 226s - 4s/step - accuracy: 0.6845 - loss: 0.8279 - val_accuracy: 0.5528 - val_loss: 1.2602 - learning_rate: 0.0015
Epoch 7/30
51/51 - 228s - 4s/step - accuracy: 0.7354 - loss: 0.7524 - val_accuracy: 0.5700 - val_loss: 1.1657 - learning

              precision    recall  f1-score   support

      glioma      1.000     0.575     0.730       134
  meningioma      0.724     0.231     0.350        91
    no_tumor      0.779     0.925     0.846        80
   pituitary      0.495     1.000     0.662       102

    accuracy                          0.673       407
   macro avg      0.750     0.683     0.647       407
weighted avg      0.768     0.673     0.651       407



##### Which hyperparameter optimization technique have you used and why?

Answer Here.

**Random Search** (+ **Stratified-Group K-Fold cross-validation** of the winner). The search space (filters, dropout, dense width, learning rate, L2) is continuous / mixed, and for such spaces random search finds good regions with far fewer expensive trials than a grid. Deep-network trials are costly, so each trial uses a short schedule and is scored with **validation macro-F1**; the winning configuration is then cross-validated with groups = source scan so no scan appears in both training and validation folds. Bayesian optimisation (Keras Tuner / Optuna) is a natural next step.

##### Have you seen any improvement? Note down the improvement with updates Evaluation metric Score Chart.

In [66]:
# Improvement summary - Custom CNN
show_improvement("CustomCNN")

,baseline,tuned,change (pp)
accuracy,0.3784,0.6732,29.4840
precision,0.2211,0.7496,52.8425
recall,0.2996,0.6826,38.2987
f1_macro,0.2080,0.6470,43.9022
roc_auc,0.7839,0.9374,15.3469


Answer Here.

The chart and table above compare the **baseline** and **tuned** custom CNN on the same untouched test set. Read them as follows: a gain in **macro-F1 / recall** means the tuning really helped the weaker classes, while a flat or slightly negative change means the baseline architecture was already near the ceiling for a from-scratch network on ~1,600 training images - an honest, publishable result either way. The grouped-CV mean +- std printed above shows how much the score moves with the data split, which is the true uncertainty to keep in mind when comparing models.

### ML Model - 2

In [67]:
# ML Model - 2 : MobileNetV2 - Stage A: frozen ImageNet backbone + new classification head (baseline)
model_mnet_base = run_transfer_baseline("MobileNetV2")

MobileNetV2: 2.59M parameters, backbone frozen
Epoch 1/14
51/51 - 114s - 2s/step - accuracy: 0.6403 - loss: 0.9824 - val_accuracy: 0.7518 - val_loss: 0.6675 - learning_rate: 0.0010
Epoch 2/14
51/51 - 92s - 2s/step - accuracy: 0.7931 - loss: 0.5968 - val_accuracy: 0.8329 - val_loss: 0.5282 - learning_rate: 0.0010
Epoch 3/14
51/51 - 90s - 2s/step - accuracy: 0.8250 - loss: 0.4993 - val_accuracy: 0.8010 - val_loss: 0.5530 - learning_rate: 0.0010
Epoch 4/14
51/51 - 90s - 2s/step - accuracy: 0.8361 - loss: 0.4680 - val_accuracy: 0.7887 - val_loss: 0.5692 - learning_rate: 0.0010
Epoch 5/14

Epoch 5: ReduceLROnPlateau reducing learning rate to 0.0005000000237487257.
51/51 - 89s - 2s/step - accuracy: 0.8527 - loss: 0.4429 - val_accuracy: 0.7715 - val_loss: 0.6388 - learning_rate: 0.0010
Epoch 6/14
51/51 - 90s - 2s/step - accuracy: 0.8594 - loss: 0.4208 - val_accuracy: 0.8624 - val_loss: 0.4659 - learning_rate: 5.0000e-04
Epoch 7/14
51/51 - 90s - 2s/step - accuracy: 0.8717 - loss: 0.4081 - val_

#### 1. Explain the ML Model used and it's performance using Evaluation metric Score Chart.

**MobileNetV2 (transfer learning).** A lightweight ImageNet-pretrained backbone built on inverted residual blocks with depth-wise separable convolutions (about 2.3 M backbone parameters), chosen for **accuracy per MB and low latency** - the profile needed for a deployable web app. The backbone is frozen, `[-1, 1]` scaling is applied inside the model, and a new head (`GAP -> Dropout -> Dense(256) -> Dropout -> Dense(4)`) is trained. Because the pretrained filters (edges, textures, shapes) transfer to MRI even though ImageNet contains no medical images, this typically converges in a handful of epochs.

In [68]:
# Visualizing evaluation Metric Score chart

# Visualizing evaluation Metric Score chart - MobileNetV2 (baseline)
plot_history("MobileNetV2", "baseline")
plot_eval("MobileNetV2", "baseline")

              precision    recall  f1-score   support

      glioma      0.923     0.806     0.861       134
  meningioma      0.656     0.648     0.652        91
    no_tumor      0.904     0.825     0.863        80
   pituitary      0.803     1.000     0.891       102

    accuracy                          0.823       407
   macro avg      0.821     0.820     0.817       407
weighted avg      0.829     0.823     0.822       407



#### 2. Cross- Validation & Hyperparameter Tuning

In [69]:
# ML Model - 1 Implementation with hyperparameter optimization techniques (i.e., GridSearch CV, RandomSearch CV, Bayesian Optimization etc.)

# Fit the Algorithm

# Predict on the model

# ML Model - 2 with hyper-parameter optimisation:
#   (a) random search + grouped K-fold CV of the head on cached embeddings
#   (b) phase-1 training of the tuned head, (c) phase-2 fine-tuning of the top backbone layers at lr = 1e-5
model_mnet_tuned = tune_transfer("MobileNetV2")
plot_history("MobileNetV2", "tuned"); plot_eval("MobileNetV2", "tuned")

MobileNetV2: cached embeddings (2036, 1280) in 92s


,units,dropout,lr,l2,cv_macro_f1,cv_std
0,512,0.3,0.0009,0.000,0.9070,0.0147
1,256,0.3,0.0009,0.001,0.9040,0.0160
2,512,0.2,0.0004,0.001,0.9009,0.0116
3,256,0.2,0.0011,0.001,0.9002,0.0283
4,256,0.5,0.0018,0.001,0.8997,0.0259


Best head: {'units': 512, 'dropout': 0.3, 'lr': 0.0008920433046161788, 'l2': 1e-05} | CV macro-F1 0.907 +- 0.015
Epoch 1/10
51/51 - 106s - 2s/step - accuracy: 0.6679 - loss: 0.8886 - val_accuracy: 0.7690 - val_loss: 0.6567 - learning_rate: 8.9204e-04
Epoch 2/10
51/51 - 93s - 2s/step - accuracy: 0.7980 - loss: 0.5682 - val_accuracy: 0.8403 - val_loss: 0.4575 - learning_rate: 8.9204e-04
Epoch 3/10
51/51 - 94s - 2s/step - accuracy: 0.8269 - loss: 0.5083 - val_accuracy: 0.7813 - val_loss: 0.6251 - learning_rate: 8.9204e-04
Epoch 4/10
51/51 - 100s - 2s/step - accuracy: 0.8220 - loss: 0.4488 - val_accuracy: 0.8428 - val_loss: 0.4363 - learning_rate: 8.9204e-04
Epoch 5/10
51/51 - 118s - 2s/step - accuracy: 0.8582 - loss: 0.4038 - val_accuracy: 0.8108 - val_loss: 0.5099 - learning_rate: 8.9204e-04
Epoch 6/10
51/51 - 106s - 2s/step - accuracy: 0.8496 - loss: 0.4096 - val_accuracy: 0.8010 - val_loss: 0.5554 - learning_rate: 8.9204e-04
Epoch 7/10

Epoch 7: ReduceLROnPlateau reducing learning rate

              precision    recall  f1-score   support

      glioma      0.959     0.866     0.910       134
  meningioma      0.772     0.670     0.718        91
    no_tumor      0.900     0.900     0.900        80
   pituitary      0.803     1.000     0.891       102

    accuracy                          0.862       407
   macro avg      0.858     0.859     0.855       407
weighted avg      0.866     0.862     0.860       407



##### Which hyperparameter optimization technique have you used and why?

Answer Here.

**Random Search with Stratified-Group K-Fold CV on cached embeddings**, followed by **two-phase fine-tuning**. With a frozen backbone the 1,280-d embeddings never change, so they are computed once and dozens of head configurations (units, dropout, learning rate, L2) can be cross-validated in seconds - a very cheap way to get *real* cross-validation for a deep model. The best head is then trained and the top 30 backbone layers are unfrozen (BatchNorm kept frozen) with a 100x smaller learning rate so the pretrained features adapt to MRI without being destroyed.

##### Have you seen any improvement? Note down the improvement with updates Evaluation metric Score Chart.

In [70]:
# Improvement summary - MobileNetV2
show_improvement("MobileNetV2")

,baseline,tuned,change (pp)
accuracy,0.8231,0.8624,3.9312
precision,0.8215,0.8585,3.7022
recall,0.8198,0.8590,3.9170
f1_macro,0.8165,0.8546,3.8054
roc_auc,0.9657,0.9729,0.7254


Answer Here.

Compare the **baseline** (frozen backbone, default head) with the **tuned** model (CV-selected head + fine-tuned top layers) in the chart above. Fine-tuning usually helps most on recall of the harder classes (meningioma vs no tumor, glioma vs meningioma) because the late layers learn MRI-specific texture. If the gain is small, the frozen features were already sufficient and the extra training time is not justified - which is itself a deployment-relevant finding.

#### 3. Explain each evaluation metric's indication towards business and the business impact pf the ML model used.

Answer Here.
**Metric -> clinical / business meaning (for all models)**

| Metric | What it tells us | Business / clinical impact |
|---|---|---|
| **Accuracy** | Share of all scans classified correctly | Easy headline number, but can hide weak classes; not used alone |
| **Precision** (per class) | When the model says "glioma", how often is it right? | Low precision -> false alarms, unnecessary follow-up scans and radiologist workload |
| **Recall / sensitivity** (per class) | Of all true gliomas, how many were found? | **Most critical:** a missed tumor delays treatment; recall of the three tumor classes is the safety metric |
| **F1 / macro-F1** | Balance of precision and recall, averaged equally over classes | Primary model-selection metric because it is robust to class imbalance |
| **ROC-AUC (OvR)** | Ranking quality independent of threshold | Shows the model can be re-thresholded (e.g. high-sensitivity triage mode) without retraining |
| **Confusion matrix** | Which classes are confused | Tells clinicians *where* to double-check (e.g. meningioma vs glioma) |
| **Latency / size** | Time and memory per scan | Determines whether the model can run on a hospital workstation or in a web app |

**Business impact of the model:** used as a *triage / second-reader* tool it can prioritise suspicious scans, shorten turnaround time and give a consistent second opinion in under-resourced settings - always with a radiologist making the final decision.

### ML Model - 3

In [71]:
# ML Model - 3 Implementation

# Fit the Algorithm

# Predict on the model

# ML Model - 3 : EfficientNetB0 - Stage A: frozen ImageNet backbone + new head (baseline)
model_eff_base = run_transfer_baseline("EfficientNetB0")

EfficientNetB0: 4.38M parameters, backbone frozen
Epoch 1/14
51/51 - 140s - 3s/step - accuracy: 0.6875 - loss: 0.8594 - val_accuracy: 0.7690 - val_loss: 0.6216 - learning_rate: 0.0010
Epoch 2/14
51/51 - 116s - 2s/step - accuracy: 0.7894 - loss: 0.5758 - val_accuracy: 0.7568 - val_loss: 0.6901 - learning_rate: 0.0010
Epoch 3/14
51/51 - 111s - 2s/step - accuracy: 0.8410 - loss: 0.4828 - val_accuracy: 0.7715 - val_loss: 0.6272 - learning_rate: 0.0010
Epoch 4/14
51/51 - 112s - 2s/step - accuracy: 0.8459 - loss: 0.4580 - val_accuracy: 0.8182 - val_loss: 0.5578 - learning_rate: 0.0010
Epoch 5/14
51/51 - 111s - 2s/step - accuracy: 0.8582 - loss: 0.4581 - val_accuracy: 0.7666 - val_loss: 0.6756 - learning_rate: 0.0010
Epoch 6/14
51/51 - 112s - 2s/step - accuracy: 0.8576 - loss: 0.4209 - val_accuracy: 0.8526 - val_loss: 0.5271 - learning_rate: 0.0010
Epoch 7/14
51/51 - 111s - 2s/step - accuracy: 0.8785 - loss: 0.3933 - val_accuracy: 0.7912 - val_loss: 0.6517 - learning_rate: 0.0010
Epoch 8/14
5

#### 1. Explain the ML Model used and it's performance using Evaluation metric Score Chart.

**EfficientNetB0 (transfer learning).** A backbone designed with compound scaling of depth, width and resolution (about 4 M backbone parameters; MBConv blocks with squeeze-and-excitation attention). It generally gives the **best accuracy-per-parameter** among the compared backbones. It contains its own normalisation layer, so raw 0-255 pixels are fed directly. The same head and the same two-phase recipe as MobileNetV2 are used so the comparison isolates the backbone.

In [72]:
# Visualizing evaluation Metric Score chart

# Visualizing evaluation Metric Score chart - EfficientNetB0 (baseline)
plot_history("EfficientNetB0", "baseline")
plot_eval("EfficientNetB0", "baseline")

              precision    recall  f1-score   support

      glioma      0.901     0.881     0.891       134
  meningioma      0.745     0.451     0.562        91
    no_tumor      0.816     0.887     0.850        80
   pituitary      0.761     1.000     0.864       102

    accuracy                          0.816       407
   macro avg      0.806     0.805     0.792       407
weighted avg      0.814     0.816     0.803       407



#### 2. Cross- Validation & Hyperparameter Tuning

In [73]:
# ML Model - 3 Implementation with hyperparameter optimization techniques (i.e., GridSearch CV, RandomSearch CV, Bayesian Optimization etc.)

# Fit the Algorithm

# Predict on the model

# ML Model - 3 with hyper-parameter optimisation (grouped-CV random search on the head + two-phase fine-tuning)
model_eff_tuned = tune_transfer("EfficientNetB0")
plot_history("EfficientNetB0", "tuned"); plot_eval("EfficientNetB0", "tuned")

EfficientNetB0: cached embeddings (2036, 1280) in 110s


,units,dropout,lr,l2,cv_macro_f1,cv_std
0,512,0.2,0.0004,0.0010,0.9101,0.0079
1,512,0.3,0.0009,0.0000,0.9044,0.0260
2,256,0.5,0.0018,0.0010,0.9009,0.0177
3,256,0.2,0.0011,0.0010,0.9005,0.0111
4,128,0.5,0.0009,0.0001,0.8994,0.0187


Best head: {'units': 512, 'dropout': 0.2, 'lr': 0.0003928053080792026, 'l2': 0.001} | CV macro-F1 0.910 +- 0.008
Epoch 1/10
51/51 - 137s - 3s/step - accuracy: 0.6961 - loss: 1.5035 - val_accuracy: 0.7715 - val_loss: 1.2794 - learning_rate: 3.9281e-04
Epoch 2/10
51/51 - 111s - 2s/step - accuracy: 0.8177 - loss: 1.1539 - val_accuracy: 0.7174 - val_loss: 1.3446 - learning_rate: 3.9281e-04
Epoch 3/10
51/51 - 113s - 2s/step - accuracy: 0.8441 - loss: 1.0506 - val_accuracy: 0.7568 - val_loss: 1.2177 - learning_rate: 3.9281e-04
Epoch 4/10
51/51 - 113s - 2s/step - accuracy: 0.8588 - loss: 0.9562 - val_accuracy: 0.7543 - val_loss: 1.1706 - learning_rate: 3.9281e-04
Epoch 5/10
51/51 - 111s - 2s/step - accuracy: 0.8686 - loss: 0.8850 - val_accuracy: 0.8182 - val_loss: 1.0071 - learning_rate: 3.9281e-04
Epoch 6/10
51/51 - 112s - 2s/step - accuracy: 0.8858 - loss: 0.8154 - val_accuracy: 0.8771 - val_loss: 0.8747 - learning_rate: 3.9281e-04
Epoch 7/10
51/51 - 111s - 2s/step - accuracy: 0.8717 - loss

              precision    recall  f1-score   support

      glioma      0.912     0.851     0.880       134
  meningioma      0.707     0.582     0.639        91
    no_tumor      0.855     0.887     0.871        80
   pituitary      0.823     1.000     0.903       102

    accuracy                          0.835       407
   macro avg      0.824     0.830     0.823       407
weighted avg      0.833     0.835     0.830       407



##### Which hyperparameter optimization technique have you used and why?

Answer Here.

The same **Random Search + Stratified-Group K-Fold CV on cached embeddings**, then **two-phase fine-tuning** (top 30 layers, BatchNorm frozen, lr = 1e-5) - identical to Model 2 so differences come from the architecture, not the tuning budget. Random search was chosen over grid search for the same efficiency reason; the grouped folds prevent augmented copies of one scan from leaking across folds.

##### Have you seen any improvement? Note down the improvement with updates Evaluation metric Score Chart.

In [74]:
# Improvement summary - EfficientNetB0
show_improvement("EfficientNetB0")

,baseline,tuned,change (pp)
accuracy,0.8157,0.8354,1.9656
precision,0.8059,0.8242,1.8291
recall,0.8047,0.8302,2.5504
f1_macro,0.7917,0.8232,3.1442
roc_auc,0.9687,0.9691,0.0344


See the chart / table above. EfficientNet is more sensitive to the learning rate and to BatchNorm handling than MobileNetV2, which is why BatchNorm layers are kept in inference mode during fine-tuning. A tuned gain on macro-F1 and recall confirms the benefit of adapting the top blocks to MRI; if the gain is marginal, the frozen embedding was already well suited to this task.

### ML Model - 4 (additional)  -  ResNet50V2
#### 1. Explain the ML Model used and it's performance using Evaluation metric Score Chart.

**ResNet50V2** (about 23.5 M backbone parameters) uses pre-activation residual blocks whose skip connections keep gradients flowing in deep networks. It is the *heavy but reliable* reference: usually strong accuracy, but 5-10x more parameters and slower inference than the mobile-class backbones. Same recipe as Models 2 and 3, `[-1, 1]` scaling inside the model.

In [75]:
# ML Model - 4 : ResNet50V2 - Stage A (baseline) + evaluation chart
model_res_base = run_transfer_baseline("ResNet50V2")
plot_history("ResNet50V2", "baseline"); plot_eval("ResNet50V2", "baseline")

94668760/94668760 ━━━━━━━━━━━━━━━━━━━━ 7s 0us/step
ResNet50V2: 24.09M parameters, backbone frozen
Epoch 1/14
51/51 - 195s - 4s/step - accuracy: 0.6759 - loss: 0.9684 - val_accuracy: 0.7912 - val_loss: 0.5482 - learning_rate: 0.0010
Epoch 2/14
51/51 - 184s - 4s/step - accuracy: 0.7882 - loss: 0.6043 - val_accuracy: 0.8403 - val_loss: 0.4915 - learning_rate: 0.0010
Epoch 3/14
51/51 - 187s - 4s/step - accuracy: 0.8521 - loss: 0.4784 - val_accuracy: 0.8600 - val_loss: 0.4886 - learning_rate: 0.0010
Epoch 4/14
51/51 - 182s - 4s/step - accuracy: 0.8459 - loss: 0.4615 - val_accuracy: 0.7985 - val_loss: 0.5507 - learning_rate: 0.0010
Epoch 5/14
51/51 - 188s - 4s/step - accuracy: 0.8441 - loss: 0.4535 - val_accuracy: 0.8698 - val_loss: 0.4160 - learning_rate: 0.0010
Epoch 6/14
51/51 - 183s - 4s/step - accuracy: 0.8723 - loss: 0.3906 - val_accuracy: 0.8649 - val_loss: 0.4433 - learning_rate: 0.0010
Epoch 7/14
51/51 - 185s - 4s/step - accuracy: 0.8643 - loss: 0.3971 - val_accuracy: 0.8821 - val_l

              precision    recall  f1-score   support

      glioma      0.932     0.918     0.925       134
  meningioma      0.868     0.648     0.742        91
    no_tumor      0.889     0.900     0.894        80
   pituitary      0.810     1.000     0.895       102

    accuracy                          0.875       407
   macro avg      0.874     0.867     0.864       407
weighted avg      0.878     0.875     0.870       407



Answer Here.

##### Have you seen any improvement?
See the baseline-vs-tuned chart above. ResNet50V2 has the largest capacity and therefore the highest risk of over-fitting a ~1,600-image training set; early stopping, dropout, L2 and frozen BatchNorm counter this. Its parameter count and latency are weighed against its accuracy in the leaderboard below.


### 1. Which Evaluation metrics did you consider for a positive business impact and why?

In [76]:
# Leaderboard of every model / stage (test metrics + efficiency) - interactive
lb = metrics_table().sort_values(["val_f1_macro", "params_M"], ascending=[False, True]).reset_index(drop=True)
display(lb[["model", "stage", "accuracy", "precision", "recall", "f1_macro", "roc_auc", "val_f1_macro", "params_M", "infer_ms", "train_min"]])
lb["label"] = lb.model + " | " + lb.stage

fig = make_subplots(rows=1, cols=2, column_widths=[0.55, 0.45], subplot_titles=("Test macro-F1 / recall / precision", "Accuracy vs latency (bubble = parameters in M)"))
for m_, colr in [("f1_macro", "#4361EE"), ("recall", "#E4572E"), ("precision", "#76B041")]:
    fig.add_trace(go.Bar(y=lb.label, x=lb[m_], orientation="h", name=m_, marker_color=colr), 1, 1)
fig.add_trace(go.Scatter(x=lb.infer_ms, y=lb.accuracy, mode="markers+text", text=lb.label, textposition="top center", showlegend=False,
                         marker=dict(size=np.clip(lb.params_M * 4, 10, 70), color=lb.f1_macro, colorscale="Viridis", showscale=True,
                                     colorbar=dict(title="macro-F1", x=1.02), opacity=0.8)), 1, 2)
fig.add_hline(y=META_ACC, line_dash="dot", line_color="grey", row=1, col=2, annotation_text="metadata-only RF baseline")
fig.update_yaxes(autorange="reversed", row=1, col=1)
fig.update_xaxes(title_text="score", row=1, col=1); fig.update_xaxes(title_text="inference ms / image", row=1, col=2)
fig.update_yaxes(title_text="test accuracy", row=1, col=2)
fig.update_layout(title="Model comparison leaderboard", height=640, barmode="group", legend=dict(orientation="h", y=-0.15))
fig.show()
lb.to_csv(ARTIFACTS / "leaderboard.csv", index=False)

,model,stage,accuracy,precision,recall,f1_macro,roc_auc,val_f1_macro,params_M,infer_ms,train_min
0,ResNet50V2,baseline,0.8747,0.8745,0.8666,0.8640,0.9760,0.8883,24.0904,111.9891,43.0830
1,MobileNetV2,tuned,0.8624,0.8585,0.8590,0.8546,0.9729,0.8809,2.9159,50.1992,39.0064
2,EfficientNetB0,tuned,0.8354,0.8242,0.8302,0.8232,0.9691,0.8603,4.7075,67.1589,41.7017
3,MobileNetV2,baseline,0.8231,0.8215,0.8198,0.8165,0.9657,0.8518,2.5869,57.2655,21.7401
4,EfficientNetB0,baseline,0.8157,0.8059,0.8047,0.7917,0.9687,0.8461,4.3785,65.4929,26.8190
5,CustomCNN,tuned,0.6732,0.7496,0.6826,0.6470,0.9374,0.6607,0.6486,25.3696,406.8844
6,CustomCNN,baseline,0.3784,0.2211,0.2996,0.2080,0.7839,0.2067,1.1626,46.6268,44.4972


Answer Here.

**Metrics considered and why**
- **Macro-F1 (primary selection metric)** - treats all four classes equally, balances false alarms and misses, and is not inflated by the larger glioma class.
- **Per-class recall of the three tumor classes (safety metric)** - a missed tumor is the costly error in a clinical setting, so recall is inspected class by class in the confusion matrices.
- **Precision** - controls false alarms and radiologist workload.
- **ROC-AUC (one-vs-rest)** - checks ranking quality so an operating point can be tuned later (e.g. high-sensitivity triage).
- **Efficiency (parameters, latency, size)** - decides whether the model fits a web app / hospital workstation.
- **Accuracy** is reported for readability only; the tuning and selection use validation macro-F1, **never the test set**.

### 2. Which ML model did you choose from the above created models as your final prediction model and why?

In [77]:
# Choose the final model on VALIDATION macro-F1 (tie-break: fewer parameters); report its untouched TEST scores
cands = pd.DataFrame([v["metrics"] for v in RESULTS.values()])
cands = cands.sort_values(["val_f1_macro", "params_M"], ascending=[False, True]).reset_index(drop=True)
top = cands.iloc[0]
close = cands[cands.val_f1_macro >= top.val_f1_macro - 0.005].sort_values("params_M")          # within 0.5 pp -> prefer the lighter model
final = close.iloc[0]
FINAL_NAME, FINAL_STAGE = final.model, final.stage
final_model = MODELS[(FINAL_NAME, FINAL_STAGE)]
display(Markdown(f"### Selected model: **{FINAL_NAME} ({FINAL_STAGE})**  \n"
                 f"Validation macro-F1 {final.val_f1_macro:.3f} | **test accuracy {final.accuracy:.3f}** | test macro-F1 {final.f1_macro:.3f} | "
                 f"macro recall {final.recall:.3f} | ROC-AUC {final.roc_auc:.3f} | {final.params_M:.1f} M parameters | {final.infer_ms:.1f} ms / image  \n"
                 f"Metadata-only Random-Forest baseline for reference: accuracy {META_ACC:.3f}."))
plot_eval(FINAL_NAME, FINAL_STAGE)

### Selected model: **ResNet50V2 (baseline)**  
Validation macro-F1 0.888 | **test accuracy 0.875** | test macro-F1 0.864 | macro recall 0.867 | ROC-AUC 0.976 | 24.1 M parameters | 112.0 ms / image  
Metadata-only Random-Forest baseline for reference: accuracy 0.807.

              precision    recall  f1-score   support

      glioma      0.932     0.918     0.925       134
  meningioma      0.868     0.648     0.742        91
    no_tumor      0.889     0.900     0.894        80
   pituitary      0.810     1.000     0.895       102

    accuracy                          0.875       407
   macro avg      0.874     0.867     0.864       407
weighted avg      0.878     0.875     0.870       407



Answer Here.

**Selection rule (applied automatically in the cell above):** the model with the highest **validation macro-F1** wins; if several models are within 0.5 percentage points, the **lightest** one is chosen, because a tiny, statistically meaningless gain does not justify 5-10x more parameters and slower inference in a web app. Using validation (not test) data for the decision keeps the test set an honest, one-shot estimate of real-world performance.

**Why this is the right trade-off:** in a medical triage setting the priorities are (1) high recall on tumor classes, (2) stable behaviour across data splits (CV std), (3) explainable attention (Grad-CAM) and (4) deployability. Transfer-learning models normally win on (1)-(2) with only ~1,600 training images, the custom CNN is the transparent baseline, and efficiency decides among close competitors.

### 3. Explain the model which you have used and the feature importance using any model explainability tool?

In [80]:
def make_gradcam(model, img, layer_name, class_index=None):
    # Replay the (linear) model layer by layer so the target activation is on the tape.
    # Works for nested backbones (MobileNetV2/EfficientNetB0/ResNet50V2) and the custom CNN.
    x = tf.convert_to_tensor(img[None].astype("float32"))
    with tf.GradientTape() as tape:
        conv = None
        for lyr in model.layers:
            if isinstance(lyr, keras.layers.InputLayer):
                continue
            x = lyr(x, training=False)
            if lyr.name == layer_name:
                conv = x
                tape.watch(conv)
        preds = x
        idx = int(tf.argmax(preds[0])) if class_index is None else int(class_index)
        score = preds[:, idx]
    grads = tape.gradient(score, conv)
    w = tf.reduce_mean(grads, axis=(1, 2), keepdims=True)
    cam = tf.nn.relu(tf.reduce_sum(w * conv, axis=-1))[0].numpy()
    return cam / (cam.max() + 1e-8), idx, preds[0].numpy()

In [81]:
# Explainability with Grad-CAM for the final model: correct predictions + the most confident mistakes
layer_name = gradcam_layer(FINAL_NAME)
pred_test = RESULTS[(FINAL_NAME, FINAL_STAGE)]["y_pred"]; proba_test = RESULTS[(FINAL_NAME, FINAL_STAGE)]["proba"]
rng = np.random.default_rng(SEED)

def pick(cls, correct, k=1):
    idx = np.where((y_test == cls) & ((pred_test == cls) == correct))[0]
    return list(rng.choice(idx, min(k, len(idx)), replace=False)) if len(idx) else []

chosen = [i for c in range(N_CLASSES) for i in pick(c, True, 1)]
wrong = np.where(pred_test != y_test)[0]
chosen += list(wrong[np.argsort(-proba_test[wrong].max(1))][:4])        # most confident errors
n = len(chosen)
fig = make_subplots(rows=2, cols=max(n, 1), vertical_spacing=0.04, horizontal_spacing=0.004,
                    subplot_titles=[f"true: {CLASS_NAMES[y_test[i]]}<br>pred: {CLASS_NAMES[pred_test[i]]} ({proba_test[i].max():.0%})" for i in chosen])
for col, i in enumerate(chosen, 1):
    cam, _, _ = make_gradcam(final_model, X_test[i], layer_name)
    fig.add_trace(go.Image(z=X_test[i]), row=1, col=col)
    fig.add_trace(go.Image(z=overlay_cam(X_test[i], cam)), row=2, col=col)
fig.update_xaxes(visible=False); fig.update_yaxes(visible=False)
fig.update_layout(title=f"Grad-CAM ({FINAL_NAME}) - top row: MRI, bottom row: where the model looks (red = most influential); last columns = confident errors",
                  height=520, margin=dict(t=110))
fig.show()

Answer Here.

**Model and explainability.** The final model is a CNN (custom or a fine-tuned ImageNet backbone, see the selection cell) that maps a 224x224 MRI to four class probabilities. Because deep networks are black boxes, **Grad-CAM** is used: it back-propagates the predicted-class score to the last convolutional feature maps, weights each map by the average gradient and shows the result as a heatmap over the MRI.

**How to read the heatmaps (the validation that matters):**
- Healthy behaviour: red regions sit on **brain tissue / the lesion** (for pituitary: the sellar region at the skull base).
- Warning signs: red on the **black background, the skull edge or image borders** would mean the model uses framing / acquisition shortcuts - the risk quantified in Charts 5-13 and the metadata-only baseline.
- The last columns show the model's **most confident mistakes**; inspecting them tells clinicians and engineers which anatomy / classes need more data.

Feature importance in the classical sense does not exist for raw pixels; Grad-CAM (pixel-region importance) plus the metadata-only baseline are the appropriate substitutes.

## ***8.*** ***Future Work (Optional)***

### 1. Save the best performing ml model in a pickle file or joblib file format for deployment process.


In [82]:
# Save the File
# Save the best performing model (.h5) + metadata (joblib/json), plus every tuned model and the Streamlit app files
BEST_PATH = MODELS_DIR / "best_model.h5"
final_model.save(BEST_PATH)
for (nm, stg), mdl in MODELS.items():
    if stg == "tuned":
        mdl.save(MODELS_DIR / f"{nm}_tuned.h5")

meta = dict(model_name=FINAL_NAME, stage=FINAL_STAGE, img_size=int(IMG_SIZE), class_names=CLASS_NAMES,
            last_conv_layer=gradcam_layer(FINAL_NAME),
            metrics={k: float(final[k]) for k in ["accuracy", "precision", "recall", "f1_macro", "roc_auc", "val_f1_macro", "params_M", "infer_ms"]})
(MODELS_DIR / "model_meta.json").write_text(json.dumps(meta, indent=2))
joblib.dump(meta, MODELS_DIR / "model_meta.joblib")                  # pickle-style artefact for non-Keras tooling

# Streamlit app + requirements (run with:  streamlit run app.py)
APP_CODE = r"""# Brain Tumor MRI Classifier - Streamlit app
# Run:  streamlit run app.py   (expects artifacts/models/best_model.h5 + model_meta.json created by the notebook)
import json
import os
from pathlib import Path

import numpy as np
import plotly.graph_objects as go
import streamlit as st
from PIL import Image

st.set_page_config(page_title="Brain Tumor MRI Classifier", page_icon="🧠", layout="wide")
MODEL_DIR = Path(os.environ.get("MRI_MODEL_DIR", "artifacts/models"))
COLORS = ["#E4572E", "#17BEBB", "#76B041", "#4361EE"]
INFO = {
    "glioma": "Tumor arising from glial cells; often irregular and infiltrative.",
    "meningioma": "Usually benign tumor of the meninges, typically well-defined and attached to the dura.",
    "pituitary": "Tumor of the pituitary gland located at the skull base (sella region).",
    "no_tumor": "No tumor pattern detected by the model.",
}


@st.cache_resource(show_spinner="Loading model...")
def load_model():
    from tensorflow import keras

    meta = json.loads((MODEL_DIR / "model_meta.json").read_text())
    model = keras.models.load_model(MODEL_DIR / "best_model.h5", compile=False)
    return model, meta


def preprocess(image, size):
    # same geometry as training: RGB, size x size, raw 0-255 floats (scaling happens inside the model)
    return np.asarray(image.convert("RGB").resize((size, size), Image.BILINEAR), dtype="float32")


def gradcam(model, arr, layer_name):
    import tensorflow as tf
    from tensorflow import keras

    layer = model.get_layer(layer_name)
    grad_model = keras.Model(model.inputs, [layer.output, model.output])
    with tf.GradientTape() as tape:
        conv, preds = grad_model(tf.convert_to_tensor(arr[None]), training=False)
        idx = int(tf.argmax(preds[0]))
        score = preds[:, idx]
    grads = tape.gradient(score, conv)
    weights = tf.reduce_mean(grads, axis=(1, 2), keepdims=True)
    cam = tf.nn.relu(tf.reduce_sum(weights * conv, axis=-1))[0].numpy()
    return cam / (cam.max() + 1e-8)


def overlay(arr, cam, alpha=0.45):
    import matplotlib.pyplot as plt

    img = arr.astype(np.uint8)
    cam_r = np.asarray(Image.fromarray((cam * 255).astype(np.uint8)).resize(img.shape[1::-1], Image.BILINEAR)) / 255.0
    heat = (plt.get_cmap("jet")(cam_r)[..., :3] * 255).astype(np.uint8)
    return ((1 - alpha) * img + alpha * heat).astype(np.uint8)


st.title("🧠 Brain Tumor MRI Classifier")
st.caption("Deep-learning decision support: glioma · meningioma · pituitary · no tumor")

try:
    model, meta = load_model()
except Exception as exc:  # friendly message instead of a stack trace
    st.error("Model files not found. Run the notebook first (it creates artifacts/models/best_model.h5 and model_meta.json).")
    st.code(str(exc))
    st.stop()

classes = meta["class_names"]
with st.sidebar:
    st.header("About the model")
    st.write(f"**Architecture:** {meta['model_name']} ({meta['stage']})")
    st.write(f"**Input size:** {meta['img_size']}x{meta['img_size']}")
    m = meta.get("metrics", {})
    if m:
        st.metric("Test accuracy", f"{m.get('accuracy', 0):.1%}")
        st.metric("Test macro-F1", f"{m.get('f1_macro', 0):.3f}")
    show_cam = st.toggle("Show Grad-CAM explanation", value=True)
    threshold = st.slider("Low-confidence threshold", 0.3, 0.9, 0.6, 0.05)
    st.warning("Research prototype - NOT a medical device. Results must be reviewed by a qualified radiologist.")

upload = st.file_uploader("Upload a brain MRI image (JPG / PNG)", type=["jpg", "jpeg", "png"])
if upload is None:
    st.info("Upload an MRI slice to get a prediction, class probabilities and a Grad-CAM explanation.")
    st.stop()

image = Image.open(upload)
arr = preprocess(image, meta["img_size"])
probs = model.predict(arr[None], verbose=0)[0]
top = int(np.argmax(probs))
label, conf = classes[top], float(probs[top])

left, mid, right = st.columns([1, 1, 1.2])
with left:
    st.subheader("Uploaded MRI")
    st.image(image, use_container_width=True)
with mid:
    st.subheader("Prediction")
    st.metric("Predicted class", label.replace("_", " ").title(), f"{conf:.1%} confidence")
    st.progress(min(conf, 1.0))
    st.write(INFO.get(label, ""))
    if conf < threshold:
        st.warning("Low confidence - please obtain a specialist review.")
with right:
    st.subheader("Class probabilities")
    fig = go.Figure(go.Bar(x=[float(p) for p in probs], y=[c.replace("_", " ") for c in classes], orientation="h",
                           marker_color=COLORS[: len(classes)], text=[f"{p:.1%}" for p in probs], textposition="outside"))
    fig.update_layout(height=300, xaxis=dict(range=[0, 1.1], title="probability"), margin=dict(l=0, r=0, t=10, b=0))
    st.plotly_chart(fig, use_container_width=True)

if show_cam:
    st.subheader("Where the model is looking (Grad-CAM)")
    try:
        cam = gradcam(model, arr, meta["last_conv_layer"])
        c1, c2 = st.columns(2)
        c1.image(arr.astype(np.uint8), caption="Input", use_container_width=True)
        c2.image(overlay(arr, cam), caption="Grad-CAM overlay (red = most influential)", use_container_width=True)
    except Exception as exc:
        st.info(f"Grad-CAM not available for this model: {exc}")
"""
Path("app.py").write_text(APP_CODE, encoding="utf-8")
Path("requirements.txt").write_text("tensorflow>=2.12\nstreamlit>=1.32\nplotly>=5.18\nnumpy\npandas\npillow\nscipy\nscikit-learn\nmatplotlib\njoblib\n")

files = sorted(MODELS_DIR.glob("*.h5")) + [MODELS_DIR / "model_meta.json", MODELS_DIR / "model_meta.joblib", ARTIFACTS / "leaderboard.csv", Path("app.py")]
display(pd.DataFrame({"file": [str(f) for f in files], "size_MB": [round(f.stat().st_size / 1e6, 2) for f in files]}))
print("Best model saved ->", BEST_PATH)

,file,size_MB
0,artifacts\models\best_model.h5,100.97
1,artifacts\models\CustomCNN_baseline.weights.h5,14.05
2,artifacts\models\CustomCNN_tuned.h5,7.91
3,artifacts\models\CustomCNN_tuned.weights.h5,7.88
4,artifacts\models\EfficientNetB0_baseline.weigh...,20.79
5,artifacts\models\EfficientNetB0_tuned.h5,36.46
6,artifacts\models\EfficientNetB0_tuned_ft.weigh...,36.61
7,artifacts\models\EfficientNetB0_tuned_head.wei...,24.74
8,artifacts\models\MobileNetV2_baseline.weights.h5,13.43
9,artifacts\models\MobileNetV2_tuned.h5,29.41


Best model saved -> artifacts\models\best_model.h5


### 2. Again Load the saved model file and try to predict unseen data for a sanity check.


In [83]:
# Load the File and predict unseen data.
# Load the saved model file again and predict unseen test images (sanity check for deployment)
reloaded = keras.models.load_model(BEST_PATH, compile=False)
meta2 = json.loads((MODELS_DIR / "model_meta.json").read_text())

def predict_image(path, model=reloaded, meta=meta2):
    """Same function the deployed app uses: file path -> class, confidence, all probabilities."""
    arr = load_rgb(path, meta["img_size"]).astype("float32")
    p = model.predict(arr[None], verbose=0)[0]
    return dict(prediction=meta["class_names"][int(p.argmax())], confidence=float(p.max()),
                probabilities={c: round(float(v), 4) for c, v in zip(meta["class_names"], p)})

idx = np.random.default_rng(1).choice(len(te_df), size=min(8, len(te_df)), replace=False)
rows_ = []
for i in idx:
    r = predict_image(te_df.path[i])
    rows_.append(dict(file=te_df.filename[i][:28], true=te_df.label[i], predicted=r["prediction"],
                      confidence=round(r["confidence"], 3), correct=r["prediction"] == te_df.label[i]))
display(pd.DataFrame(rows_))

# The reloaded model must reproduce the in-memory model on the whole test set
p_mem = final_model.predict(make_ds(X_test), verbose=0); p_new = reloaded.predict(make_ds(X_test), verbose=0)
agree = float((p_mem.argmax(1) == p_new.argmax(1)).mean())
print(f"Prediction agreement between in-memory and re-loaded model: {agree:.1%} | max prob. difference {np.abs(p_mem - p_new).max():.2e}")
assert agree >= 0.99, "re-loaded model disagrees with the trained model"
print("Sanity check passed - the saved model is ready for the Streamlit app (streamlit run app.py).")

,file,true,predicted,confidence,correct
0,Tr-no_0142_jpg.rf.e799e05d5f,no_tumor,no_tumor,0.958,True
1,Tr-me_0471_jpg.rf.ae697c7402,meningioma,meningioma,0.644,True
2,Tr-me_0044_jpg.rf.0223369274,meningioma,meningioma,0.514,True
3,Tr-no_0218_jpg.rf.5467165d3e,no_tumor,no_tumor,1.000,True
4,Tr-gl_0066_jpg.rf.2c55f529ce,glioma,glioma,0.995,True
5,Tr-gl_0134_jpg.rf.11681389f2,glioma,glioma,0.998,True
6,Tr-pi_0466_jpg.rf.0c965ef783,pituitary,pituitary,1.000,True
7,Tr-no_0070_jpg.rf.65acf02ff9,no_tumor,no_tumor,0.890,True


Prediction agreement between in-memory and re-loaded model: 100.0% | max prob. difference 0.00e+00
Sanity check passed - the saved model is ready for the Streamlit app (streamlit run app.py).


### ***Congrats! Your model is successfully created and ready for deployment on a live server for a real user interaction !!!***

# **Conclusion**

In [84]:
# Final scoreboard (generated from this run)
best_rows = metrics_table().sort_values("val_f1_macro", ascending=False)
display(Markdown(
    f"**Final model: {FINAL_NAME} ({FINAL_STAGE})** - test accuracy **{final.accuracy:.1%}**, macro-F1 **{final.f1_macro:.3f}**, "
    f"macro recall {final.recall:.3f}, ROC-AUC {final.roc_auc:.3f}, {final.params_M:.1f} M parameters, {final.infer_ms:.1f} ms/image.  \n"
    f"Metadata-only Random-Forest baseline: {META_ACC:.1%} accuracy -> the deep model adds **{(final.accuracy - META_ACC) * 100:+.1f} percentage points**.  \n"
    f"Evaluation uses a leakage-free split ({len(te_df)} test images, 0 shared source scans)."))
fig = px.bar(best_rows.assign(label=best_rows.model + " | " + best_rows.stage), x="label", y="f1_macro", color="stage",
             text=best_rows.f1_macro.round(3), title="Test macro-F1 of every trained model")
fig.add_hline(y=META_F1, line_dash="dot", annotation_text="metadata-only baseline")
fig.update_layout(height=420, xaxis_title="", yaxis_title="macro-F1"); fig.show()

**Final model: ResNet50V2 (baseline)** - test accuracy **87.5%**, macro-F1 **0.864**, macro recall 0.867, ROC-AUC 0.976, 24.1 M parameters, 112.0 ms/image.  
Metadata-only Random-Forest baseline: 80.7% accuracy -> the deep model adds **+6.7 percentage points**.  
Evaluation uses a leakage-free split (407 test images, 0 shared source scans).

Write the conclusion here.

**What was built.** A complete, reproducible deep-learning pipeline for 4-class brain-MRI classification: data audit and EDA with 15 interactive charts, three statistical hypothesis tests, a leakage-safe split, a custom CNN versus three fine-tuned ImageNet backbones, cross-validated hyper-parameter search, a leaderboard, Grad-CAM explanations, a saved `.h5` model and a Streamlit app (`app.py`).

**Key findings**
1. **The data hides two traps.** (a) The vendor's split leaks: 164 source scans occur in more than one split and 27 % of its test images have a sibling in training. A group-aware re-split removes the leakage, so the reported numbers are an honest estimate. (b) The classes differ strongly in global brightness, foreground coverage and sharpness - a Random Forest on six trivial statistics already scores ~80 %+. Deep models are only meaningful if they clearly beat that baseline *and* look at tissue in Grad-CAM.
2. **Transfer learning vs scratch.** With only ~1,600 training images, pretrained backbones converge faster and usually generalise better than the custom CNN; the scoreboard above quantifies the gap for this run. Fine-tuning gains are reported as baseline-vs-tuned deltas rather than assumed.
3. **Model choice is multi-criteria**: validation macro-F1 first, recall of tumor classes as the safety lens, then size and latency - the lightest model within 0.5 pp of the best is preferred for deployment.

**Business impact.** Triage prioritisation, second-opinion support in under-resourced settings and cohort segmentation for research; the Streamlit app shows the class, confidence, probabilities and an explanation so a clinician can judge the output instead of trusting a black box.

**Limitations and next steps**
- Single public dataset, 2-D slices, no patient IDs: external multi-centre validation and patient-level splitting are required before any clinical claim.
- Probability calibration (temperature scaling) and an 'uncertain - refer to specialist' band; test-time augmentation and ensembling.
- Tumor segmentation / localisation (e.g. U-Net) and 3-D models; Bayesian hyper-parameter search; MLflow experiment tracking; Docker + CI for the app.

*This is a research prototype and not a medical device.*

### ***Hurrah! You have successfully completed your Machine Learning Capstone Project !!!***